In [1]:
# import external packages
# append ../../ to make link to main repo work
import sys
sys.path.append('../')
sys.path.append('/Applications/anaconda3/envs/PhD_clean/lib/python3.11/site-packages/')


import numpy as np
import pandas as pd
import numba
from numba import vectorize
import glob # for file search
import copy
import os # operating system stuff
import re # regex
import fastparquet # fast read/write for large data structures
import sklearn.preprocessing as pre # for data normalisation
from sklearn.metrics import pairwise_distances

import geopandas as gpd
import rasterio as rio
import rasterio.mask
from rasterio.plot import plotting_extent
from shapely.geometry import Polygon
from shapely.geometry.point import Point
import pyproj
from pyproj import CRS
from inpoly import inpoly2 # for fast inpolygon checks
import utm

import matplotlib.pyplot as plt 
import matplotlib.dates as mdates
from matplotlib import cm as mpl_cm
from matplotlib import colors as mcolors 

from mpl_toolkits.axes_grid1 import make_axes_locatable # for colorbar scaling
from mpl_toolkits.axes_grid1 import ImageGrid
from matplotlib_scalebar.scalebar import ScaleBar
from matplotlib.gridspec import GridSpec
from matplotlib.ticker import FormatStrFormatter

import seaborn as sns
from matplotlib import rc_file_defaults
rc_file_defaults()
# sns.set(style=None, color_codes=True)

from shapely.geometry import Polygon
from shapely.geometry.point import Point
import datetime

import configparser

from cmcrameri import cm # for scientific colourmaps

###########################
# import main local package
import SPOTSAR_main as sm


In [3]:
print(cm.vik)

In [2]:
################ Define user INPUTS #######################
######## please edit the values of this block only ########
###########################################################

# define hillshade file
HS_FILE = '../test_data/DEM/TDX_Merapi_WGS84_HS.tif'

# define lon and lat files
LON_FILE = '../test_data/CSK_dsc/geo2/20200910.lon'
LAT_FILE = '../test_data/CSK_dsc/geo2/20200910.lat'

# define parameter text file
PARAM_FILE = '../test_data/CSK_dsc/params.txt'

# define map region of interest
lon_lims = [110.425, 110.45]
lat_lims = [-7.555, -7.535]

# define colour range {min max} (min = -max)
vmax = 3 # range of colourscale in meters

# define file names for data, lon and lat
DIRECTORY_PATH = "../test_data/CSK_dsc/DISP_txt2/"
# define path to ccp and ccs files
DIRECTORY_PATH_CCS = "../test_data/CSK_dsc/CCS2/"

# Set the regular expression pattern to match the file names
PATTERN1 = r"^c20200927_c20201113_disp_[0-9]+_[0-9]+\.txt$"
PATTERN2 = r"^c20200926_c20201113_disp_[0-9]+_[0-9]+\.txt$"
PATTERN3 = r"^c20200927_c20210812_disp_[0-9]+_[0-9]+\.txt$"
PATTERN4 = r"^c20210217_c20210218_disp_[0-9]+_[0-9]+\.txt$"

# Set the regular expression pattern to match the ccs file names
PATTERN_CCS1 = r"^c20200927_c20201113_ccs_[0-9]+_[0-9]+$"
PATTERN_CCS2 = r"^c20200926_c20201113_ccs_[0-9]+_[0-9]+$"
PATTERN_CCS3 = r"^c20200927_c20210812_ccs_[0-9]+_[0-9]+$"
PATTERN_CCS4 = r"^c20210217_c20210218_ccs_[0-9]+_[0-9]+$"


# open hillshade file and re-order offset and CCS files

# open hill shade file with rasterio
DEM_HS = rio.open(HS_FILE)
SHADING = DEM_HS.read(1,masked=True) # rasterio bands are indexed from 1

# extract DEM extent
DEM_EXTENT=[DEM_HS.bounds.left,DEM_HS.bounds.right,DEM_HS.bounds.bottom,DEM_HS.bounds.top]

# read parameters from text file
config = configparser.ConfigParser()
config.read(PARAM_FILE)
WIDTH = int(config.get('params', 'width'))
LINES = int(config.get('params', 'lines'))
WIDTH_CCS = int(config.get('params', 'width_ccs'))
LINES_CCS = int(config.get('params', 'lines_ccs'))
R_START = int(config.get('params', 'r_start'))
A_START = int(config.get('params', 'a_start'))
R_STEP = int(config.get('params', 'r_step'))
A_STEP = int(config.get('params', 'a_step'))
HEADING = float(config.get('params', 'heading'))
MEAN_INC = float(config.get('params', 'mean_inc'))

In [3]:

# reorder file using Post_processing.reorder_files
matching_files1 = sm.Post_processing.reorder_files(DIRECTORY_PATH,PATTERN1,0)
matching_files_ccs1 = sm.Post_processing.reorder_files(DIRECTORY_PATH_CCS,PATTERN_CCS1,0)
matching_files2 = sm.Post_processing.reorder_files(DIRECTORY_PATH,PATTERN2,0)
matching_files_ccs2 = sm.Post_processing.reorder_files(DIRECTORY_PATH_CCS,PATTERN_CCS2,0)
matching_files3 = sm.Post_processing.reorder_files(DIRECTORY_PATH,PATTERN3,0)
matching_files_ccs3 = sm.Post_processing.reorder_files(DIRECTORY_PATH_CCS,PATTERN_CCS3,0)
matching_files4 = sm.Post_processing.reorder_files(DIRECTORY_PATH,PATTERN4,0)
matching_files_ccs4 = sm.Post_processing.reorder_files(DIRECTORY_PATH_CCS,PATTERN_CCS4,0)
matching_files5 = sm.Post_processing.reorder_files(DIRECTORY_PATH+'stor/',PATTERN4,0)
matching_files_ccs5 = sm.Post_processing.reorder_files(DIRECTORY_PATH_CCS+'stor/',PATTERN_CCS4,0)


# test if file ordering has worked
print(matching_files1)
print(matching_files_ccs1)
print(matching_files2)
print(matching_files_ccs2)
print(matching_files3)
print(matching_files_ccs3)
print(matching_files4)
print(matching_files_ccs4)
print(matching_files5)
print(matching_files_ccs5)

['c20200927_c20201113_disp_58_28.txt', 'c20200927_c20201113_disp_140_68.txt', 'c20200927_c20201113_disp_224_108.txt', 'c20200927_c20201113_disp_306_148.txt', 'c20200927_c20201113_disp_388_188.txt']
['c20200927_c20201113_ccs_58_28', 'c20200927_c20201113_ccs_140_68', 'c20200927_c20201113_ccs_224_108', 'c20200927_c20201113_ccs_306_148', 'c20200927_c20201113_ccs_388_188']
['c20200926_c20201113_disp_58_28.txt', 'c20200926_c20201113_disp_140_68.txt', 'c20200926_c20201113_disp_224_108.txt', 'c20200926_c20201113_disp_306_148.txt', 'c20200926_c20201113_disp_388_188.txt']
['c20200926_c20201113_ccs_58_28', 'c20200926_c20201113_ccs_140_68', 'c20200926_c20201113_ccs_224_108', 'c20200926_c20201113_ccs_306_148', 'c20200926_c20201113_ccs_388_188']
['c20200927_c20210812_disp_58_28.txt', 'c20200927_c20210812_disp_140_68.txt', 'c20200927_c20210812_disp_224_108.txt', 'c20200927_c20210812_disp_306_148.txt', 'c20200927_c20210812_disp_388_188.txt']
['c20200927_c20210812_ccs_58_28', 'c20200927_c20210812_ccs_1

In [4]:

# load data from files into class multi-kernel
example_pairs = []
i = 0
for (matching_files,matching_files_ccs) in zip([matching_files1,matching_files2,matching_files3,matching_files4,matching_files5],[matching_files_ccs1,matching_files_ccs2,matching_files_ccs3,matching_files_ccs4,matching_files_ccs5]):
    if i==4:
        datastack = sm.Post_processing.MultiKernel(DIRECTORY_PATH+'stor/',
                                                matching_files,
                                                DIRECTORY_PATH_CCS+'stor/',
                                                matching_files_ccs,
                                                LAT_FILE,
                                                LON_FILE,
                                                HEADING,
                                                MEAN_INC,
                                                LINES_CCS,
                                                WIDTH_CCS)
    else:
        datastack = sm.Post_processing.MultiKernel(DIRECTORY_PATH,
                                                matching_files,
                                                DIRECTORY_PATH_CCS,
                                                matching_files_ccs,
                                                LAT_FILE,
                                                LON_FILE,
                                                HEADING,
                                                MEAN_INC,
                                                LINES_CCS,
                                                WIDTH_CCS)

    # We need to assign some data not stored in the disp.txt files.
    datastack.get_params_from_file_name()
    datastack.get_latlon_from_file(WIDTH)
    datastack.add_lat_lon_to_data(R_START,A_START)
    datastack.crop_stack_ccs(R_STEP,A_STEP)
    # the object datastack now has several attributes associated with the whole dataset (e.g., date1, date2, heading)
    # Next we add all the offset data (disp.txt) to the stack
    stacked_data = datastack.assign_data_to_stack(R_STEP,A_STEP)
    # The attribute 'Stack' we find a list of single-kernel objects which contain the actual offset data, ccp and ccs data and the coordinates.

    # add stack to list
    example_pairs.append(datastack)
    i +=1


In [5]:
# lava flow files:
L1888_FILE = '/Users/tz20896/Documents/PhD/projects/Merapi2021/merapi_maps/L1888_v2.shp'
L1948_FILE = '/Users/tz20896/Documents/PhD/projects/Merapi2021/merapi_maps/L1948.shp'
L1956_FILE = '/Users/tz20896/Documents/PhD/projects/Merapi2021/merapi_maps/L1956.shp'
L1992_FILE = '/Users/tz20896/Documents/PhD/projects/Merapi2021/merapi_maps/L1992.shp'
L1997_FILE = '/Users/tz20896/Documents/PhD/projects/Merapi2021/merapi_maps/L1997.shp'
L1998_FILE = '/Users/tz20896/Documents/PhD/projects/Merapi2021/merapi_maps/L1998.shp'
CRATER_FILE = '/Users/tz20896/Documents/PhD/projects/Merapi2021/merapi_maps/Merapi_crater.shp'

# Read the shapefile
L1888 = gpd.read_file(L1888_FILE)
L1948 = gpd.read_file(L1948_FILE)
L1956 = gpd.read_file(L1956_FILE)
L1992 = gpd.read_file(L1992_FILE)
L1997 = gpd.read_file(L1997_FILE)
L1998 = gpd.read_file(L1998_FILE)
CRATER = gpd.read_file(CRATER_FILE)

# Extract latitude and longitude into separate columns
coords_L1888 = np.array(list(L1888["geometry"][0].coords))
coords_L1956_1 = np.array(list(L1956["geometry"][0].coords))
coords_L1956_2 = np.array(list(L1956["geometry"][1].coords))
coords_L1948 = np.array(list(L1948["geometry"][0].coords))
coords_L1992 = np.array(list(L1992["geometry"][0].coords))
coords_L1997 = np.array(list(L1997["geometry"][0].coords))
coords_L1998 = np.array(list(L1998["geometry"][0].coords))
coords_CRATER = np.array(list(CRATER["geometry"][0].coords))

In [6]:
%matplotlib osx
plt.rcParams.update({
    "text.usetex": False,
})
# visualise displacement magnitude vectors
lon_lims = [110.435, 110.441]
lat_lims = [-7.539, -7.5345]
max_mag = 5 
width = 0.01
qk_length = 5
step = 2
scale = 50
# fig, ax = sm.plot.plot_vec_attr(example_pairs[0].Stack[1],'Mag',step,scale,width=width,attr_lims=[0,max_mag],qk_length=qk_length,shading=SHADING,dem_extent=DEM_EXTENT,lat_lims=lat_lims,lon_lims=lon_lims)
# fig, ax = sm.plot.plot_vec_attr(example_pairs[0].Stack[1],'Mag',step,scale,width=width,attr_lims=[0,max_mag],qk_length=qk_length,lat_lims=lat_lims,lon_lims=lon_lims)
# ax.plot(coords_L1888[:,0],coords_L1888[:,1],linewidth=2,color='tab:red',label='L1888')
# ax.set_xlabel(r'Longitude (°E)')
# ax.set_ylabel(r'Latitude (°N)')
# ax.set_aspect('equal')

In [ ]:
# make amplitude plot(s)

fig, ax = plt.subplots(1,1)

for obj in example_pairs[0].Stack:
    ax.

In [8]:
import h5py
med_filt_radius = 7
median_list_list = []
for multi_kernel_obj in example_pairs[0:-1]:
    median_list = []
    for obj in multi_kernel_obj.Stack:
        h5_file = f'../test_data/CSK_dsc/hdf5_files/{obj.Name[0:-4]}_outlier_detected_med_2_new.h5'
        print('do med filt',med_filt_radius)
        f = h5py.File(h5_file,'a')
        R_off_med_diff, A_off_med_diff, mag_off_med_diff = obj.run_med_filt(med_filt_radius)
        obj.to_hdf5(h5_file,[f'Mag_off_med_diff_{med_filt_radius}_vec',
                                f'Mag_off_med_diff_{med_filt_radius}'])
        median_list.append(mag_off_med_diff)
    median_list_list.append(median_list)

do med filt 7


/Users/tz20896/anaconda3/envs/PhD_clean/lib/python3.8/site-packages/numpy/lib/nanfunctions.py:1217: RuntimeWarning: All-NaN slice encountered
  return function_base._ureduce(a, func=_nanmedian, keepdims=keepdims,


do med filt 7
do med filt 7
do med filt 7
do med filt 7
do med filt 7
do med filt 7
do med filt 7
do med filt 7
do med filt 7
do med filt 7
do med filt 7
do med filt 7
do med filt 7
do med filt 7
do med filt 7
do med filt 7
do med filt 7
do med filt 7
do med filt 7


In [9]:
print(dir(example_pairs[0].Stack[0]))

['A_idx', 'A_idx_vec', 'A_off', 'A_off_med_diff_7', 'A_off_med_diff_7_vec', 'A_off_vec', 'A_win', 'Ccp_off', 'Ccp_off_vec', 'Ccs_off', 'Ccs_off_vec', 'Col_index', 'Col_index_vec', 'Date1', 'Date2', 'Heading', 'Lat_off', 'Lat_off_vec', 'Lon_off', 'Lon_off_vec', 'Mag', 'Mag_off_med_diff_7', 'Mag_off_med_diff_7_vec', 'Mag_vec', 'Name', 'Nan_mask', 'Nan_mask_vec', 'Phase', 'Phase_vec', 'R_idx', 'R_idx_vec', 'R_off', 'R_off_med_diff_7', 'R_off_med_diff_7_vec', 'R_off_vec', 'R_win', 'Row_index', 'Row_index_vec', 'SNR', 'SNR_vec', 'X_off', 'X_off_vec', 'Y_off', 'Y_off_vec', '__class__', '__delattr__', '__dict__', '__dir__', '__doc__', '__eq__', '__format__', '__ge__', '__getattribute__', '__gt__', '__hash__', '__init__', '__init_subclass__', '__le__', '__lt__', '__module__', '__ne__', '__new__', '__reduce__', '__reduce_ex__', '__repr__', '__setattr__', '__sizeof__', '__str__', '__subclasshook__', '__weakref__', 'calc_Mag', 'calc_SNR', 'calc_phase', 'comp_ll_dist_matrix', 'from_hdf5', 'get_Row

In [10]:
import matplotlib.patches as mpatches
import matplotlib.transforms as mtransforms

def add_right_cax(ax, pad, width):
    axpos = ax.get_position()
    caxpos = mtransforms.Bbox.from_extents(
        axpos.x1 + pad,
        axpos.y0,
        axpos.x1 + pad + width,
        axpos.y1
    )
    cax = ax.figure.add_axes(caxpos)

    return cax

def add_bottom_cax(ax, height):
    axpos = ax.get_position()
    caxpos = mtransforms.Bbox.from_extents(
        axpos.x0,
        axpos.y0,
        axpos.x1,
        axpos.y0 + height
    )
    cax = ax.figure.add_axes(caxpos)

    return cax

def add_top_cax(ax, pad, height):
    axpos = ax.get_position()
    caxpos = mtransforms.Bbox.from_extents(
        axpos.x0,
        axpos.y1 + pad,
        axpos.x1,
        axpos.y1 + pad + height
    )
    cax = ax.figure.add_axes(caxpos)

    return cax

In [11]:
import copy
import matplotlib.pyplot as plt
import numpy as np
from matplotlib_scalebar.scalebar import ScaleBar
from matplotlib.gridspec import GridSpec

from cmcrameri import cm

import pyproj
from pyproj import CRS

def plot_vec_attr_alpha(obj,attr,step,scale,width =0.005 ,attr_lims=[0,1],qk_length=1,shading = [],dem_extent = [],lat_lims = [],lon_lims = [],alpha=0,fig_ax= []):
    """
    Plots displacement as vectors in slantrange - azimuth plane and 
    assigns colour based on attribute value and limits

    Args:
        obj (class object): _description_
        attr (str): _description_
        step (int): _description_
        scale (int): _description_
        attr_lims (list of floats, optional): _description_. Defaults to [0,1]
        qk_length (float, optional): _description_. Defaults to 1
        shading (np.array, optional): _description_. Defaults to [] -> do not use.
        dem_extent (list, optional): _description_. Defaults to [] -> do not use.
        lat_lims (list, optional): _description_. Defaults to [] -> do not use.
        lon_lims (list, optional): _description_. Defaults to [] -> do not use.
    """
    # get length of 1 deg. for scalebar

    distance_meters = sm.plot.get_1deg_dist()

    # copy data to manipulate limits without messing with the original data
    if attr != []:
        attr_copy = copy.deepcopy(getattr(obj,attr))

        # change limits for nicer plotting
        alpha_map = np.ones_like(attr_copy)
        alpha_map[attr_copy<attr_lims[0]] = alpha
        attr_copy[attr_copy<attr_lims[0]] = attr_lims[0]
        attr_copy[attr_copy>attr_lims[1]] = attr_lims[1]
        

    if lat_lims == []:
        lat_lims = [np.min(obj.Lat_off_vec),np.max(obj.Lat_off_vec)]
    
    if lon_lims == []:
        lon_lims = [np.min(obj.Lon_off_vec),np.max(obj.Lon_off_vec)]

    # plotting
    if fig_ax == []:
        fig1, ax = plt.subplots(1,1,figsize=(8,8))
    else:
        fig1 = fig_ax[0]
        ax = fig_ax[1]
        
    if (dem_extent != []):
        ax.imshow(shading,cmap=cm.grayC,alpha=0.5, extent=dem_extent)
    
    if attr == []:
        q = ax.quiver(obj.Lon_off[::step,::step],obj.Lat_off[::step,::step],
                    obj.X_off[::step,::step],obj.Y_off[::step,::step],
                    color='black',
                    alpha=alpha_map[::step,::step],
                    scale=scale, 
                    width = width, 
                    edgecolor='black',
                    linewidth=0.2,)
    else:
        q = ax.quiver(obj.Lon_off[::step,::step],obj.Lat_off[::step,::step],
                        obj.X_off[::step,::step],obj.Y_off[::step,::step],
                        attr_copy[::step,::step],
                        alpha=alpha_map[::step,::step],
                        scale=scale, 
                        width = width, 
                        edgecolor='black',
                        linewidth=0.2,
                        clim=attr_lims)
    ax.set_ylim(lat_lims)
    ax.set_xlim(lon_lims)
    ax.add_artist(ScaleBar(distance_meters,location='lower right'))
    # ax.add_artist(ScaleBar(distance_meters,location='lower right',font_properties={'size': 20}))
    # fig1.colorbar(q,ax=axes,extend='both')
    # cax = add_right_cax(ax, pad=0.02, width=0.02)
    # cbar = fig.colorbar(q, cax=cax,label='inlier probability [-]')
    ax.set_axis_off()
    # ax.set_yticks([-7.55,-7.54,-7.53])
    # ax.set_xticks([110.43, 110.44, 110.45])
    # ax.set_xticklabels(['110.43','110.44','110.45'])
    # ax.set_xlabel(r'Longitude [$^\circ$E]')
    # ax.set_ylabel(r'Latitude [$^\circ$N]')
    qk = ax.quiverkey(q,
                             0.5,
                             0.95,
                             qk_length,
                             str(qk_length) +' m displacement in slant range–azimuth plane',
                             labelpos = 'E',
                             coordinates='figure')
    # if attr != []:
    #     ax.set_title(f'{attr}: min = {np.nanmax([np.nanmin(attr_copy),attr_lims[0]]):1.3f} max = {np.nanmin([np.nanmax(attr_copy),attr_lims[1]]):1.3f}')
    return q

In [ ]:
%matplotlib osx
# import matplotlib as mpl
# mpl.rcParams.update(mpl.rcParamsDefault)
# mpl.rcParams.update({'font.size': 14})

fig, ax = plt.subplots(2,3)
alpha =0.3

for i, (obj,ax_i) in enumerate(zip(example_pairs[3].Stack,ax.ravel())):

    obj_cp = copy.deepcopy(obj)

    # get attr.
    med_diff = getattr(obj_cp,'Mag_off_med_diff_7')


    # calculate probablities
    p_in_med = 1 - med_diff/(np.nanmax(med_diff))

    # assign as attributes
    setattr(obj_cp,'p_in_med',p_in_med)


    q1 = plot_vec_attr_alpha(obj_cp,'p_in_med',5,50,0.01,[0.9,1],5,SHADING,DEM_EXTENT,[-7.545, -7.535],[110.435,110.448],alpha=alpha,fig_ax=(fig,ax_i))

a=1
cax = add_right_cax(ax[1,1], pad=0.02, width=0.02)
cbar = fig.colorbar(q1, cax=cax,label='inlier probability [-]')
ax[1,2].set_axis_off()
plt.show()
# fig.tight_layout()

In [ ]:
a=1

In [ ]:

plt.close('all')

In [10]:
# lava flow files:
L1888_FILE = '/Users/markbemelmans/Documents/PhD/projects/Merapi2021/merapi_maps/L1888_v2.shp'
L1948_FILE = '/Users/markbemelmans/Documents/PhD/projects/Merapi2021/merapi_maps/L1948.shp'
L1956_FILE = '/Users/markbemelmans/Documents/PhD/projects/Merapi2021/merapi_maps/L1956.shp'
L1992_FILE = '/Users/markbemelmans/Documents/PhD/projects/Merapi2021/merapi_maps/L1992.shp'
L1997_FILE = '/Users/markbemelmans/Documents/PhD/projects/Merapi2021/merapi_maps/L1997.shp'
L1998_FILE = '/Users/markbemelmans/Documents/PhD/projects/Merapi2021/merapi_maps/L1998.shp'
CRATER_FILE = '/Users/markbemelmans/Documents/PhD/projects/Merapi2021/merapi_maps/Merapi_crater.shp'

# Read the shapefile
L1888 = gpd.read_file(L1888_FILE)
L1948 = gpd.read_file(L1948_FILE)
L1956 = gpd.read_file(L1956_FILE)
L1992 = gpd.read_file(L1992_FILE)
L1997 = gpd.read_file(L1997_FILE)
L1998 = gpd.read_file(L1998_FILE)
CRATER = gpd.read_file(CRATER_FILE)

# Extract latitude and longitude into separate columns
coords_L1888 = np.array(list(L1888["geometry"][0].coords))
coords_L1956_1 = np.array(list(L1956["geometry"][0].coords))
coords_L1956_2 = np.array(list(L1956["geometry"][1].coords))
coords_L1948 = np.array(list(L1948["geometry"][0].coords))
coords_L1992 = np.array(list(L1992["geometry"][0].coords))
coords_L1997 = np.array(list(L1997["geometry"][0].coords))
coords_L1998 = np.array(list(L1998["geometry"][0].coords))
coords_CRATER = np.array(list(CRATER["geometry"][0].coords))

In [53]:
%matplotlib osx
plt.close('all')
p_ids = [0,1,0,1,0,1]
stack_ids = [0,0,1, 1,2,2]
fig, ax = plt.subplots(3,2,figsize=(6,6))
for i, (p_id,stack_id,a) in enumerate(zip(p_ids,stack_ids,ax.ravel())):
    mag = np.abs(example_pairs[p_id].Stack[stack_id].Mag_vec)
    med_diff = example_pairs[p_id].Stack[stack_id].Mag_off_med_diff_7
    phase = example_pairs[p_id].Stack[stack_id].Phase_vec
    print('mag')
    print(np.nanmax(mag))
    print('med_diff')
    print(np.nanmax(med_diff))
    

    # ax[i].scatter(x=phase,
    #        y=mag,
    #        s=1,alpha=0.2,marker='.')
    # ax[i].set_ylim([0.1,30])
    # ax[i].set_yscale('log')

    a.hist(med_diff.flatten(),bins=100)
    a.axvline(x=0.1*np.nanmax(med_diff),color='red')
    a.set_yscale('log')
    a.set_xlim([0,26])
    a.set_ylim([0,300000])



fig.tight_layout()

# fig, ax = plt.subplots(1,1)
# ax.scatter(x=example_pairs[2].Stack[1].Phase_vec,
#            y=example_pairs[2].Stack[1].Mag_vec,
#            s=1,alpha=0.1,marker='.')

mag
21.288221579079828
med_diff
17.24035907398683
mag
24.845967580273463
med_diff
20.06169794658468


/var/folders/m9/32v45xkn4zx6js6htb1prb2r0000gn/T/ipykernel_19998/185476870.py:26: UserWarning: Attempt to set non-positive ylim on a log-scaled axis will be ignored.
  a.set_ylim([0,300000])


mag
20.547771120002285
med_diff
19.412244183761956
mag
24.6486843462283
med_diff
24.815246447496747
mag
22.67167523585322
med_diff
22.653901429996555
mag
25.071562875098152
med_diff
23.650114693167982


In [12]:
%matplotlib osx
lon_lims = [110.428, 110.45]
lat_lims = [-7.550, -7.528]
# import cmcrameri as cm

def plot_ra_offsets(obj,shading,dem_extent,clims,grid_size=1000,lat_lims=[],lon_lims=[],cmap=cm.vik):
    # get length of 1 deg. for scalebar
    distance_meters = sm.plot.get_1deg_dist()
        # change limits for nicer plotting
    R_off = getattr(obj,'R_off')
    A_off = getattr(obj,'A_off')
    Lon_off = getattr(obj,'Lon_off')
    Lat_off = getattr(obj,'Lat_off')
    

    if lat_lims == []:
        lat_lims = [np.min(Lat_off),np.max(Lat_off)]
    
    if lon_lims == []:
        lon_lims = [np.min(Lon_off),np.max(Lon_off)]

    # plotting
    fig1, axes = plt.subplots(2,1,figsize=(8,8))
    axes[0].imshow(shading,cmap=cm.grayC,alpha=0.5, extent=dem_extent)
    axes[1].imshow(shading,cmap=cm.grayC,alpha=0.5, extent=dem_extent)

    plot_data = axes[0].hexbin(Lon_off.flatten(),Lat_off.flatten(),C=R_off.flatten(),gridsize=grid_size,cmap=cmap,vmin=clims[0],vmax=clims[1])
    axes[0].set_xlim(lon_lims)
    axes[0].set_ylim(lat_lims)
    axes[0].set_aspect('equal', 'box')
    axes[0].add_artist(ScaleBar(distance_meters,location='lower left'))
    # axes[0].set_axis_off()
    cbar = plt.colorbar(plot_data,ax=axes[0])
    cbar.set_label('Slant range offset [m]')

    plot_data = axes[1].hexbin(Lon_off.flatten(),Lat_off.flatten(),C=A_off.flatten(),gridsize=grid_size,cmap=cmap,vmin=clims[0],vmax=clims[1])
    axes[1].set_xlim(lon_lims)
    axes[1].set_ylim(lat_lims)
    axes[1].set_aspect('equal', 'box')
    axes[1].add_artist(ScaleBar(distance_meters,location='lower left'))
    # axes[0].set_axis_off()
    cbar = plt.colorbar(plot_data,ax=axes[1])
    cbar.set_label('Azimuth offset [m]')
    return fig1, axes

fig, ax = plot_ra_offsets(example_pairs[0].Stack[1],SHADING,DEM_EXTENT,[-3,3],1000,lat_lims=lat_lims,lon_lims=lon_lims,cmap=cm.vik)
ax[0].set_axis_off()
ax[1].set_axis_off()
ax[0].plot(coords_L1888[:,0],coords_L1888[:,1],linewidth=2,color='tab:blue',label='L1888')
ax[0].plot(coords_L1992[:,0],coords_L1992[:,1],linewidth=2,color='tab:pink',label='L1992')
ax[0].plot(coords_L1998[:,0],coords_L1998[:,1],linewidth=2,color='tab:green',label='L1998')
ax[0].plot(coords_CRATER[:,0],coords_CRATER[:,1],linewidth=2,color='black',linestyle='--',label='Crater rim')
ax[0].legend(loc='upper left')
ax[1].plot(coords_L1888[:,0],coords_L1888[:,1],linewidth=2,color='tab:blue')
ax[1].plot(coords_L1992[:,0],coords_L1992[:,1],linewidth=2,color='tab:pink')
ax[1].plot(coords_L1998[:,0],coords_L1998[:,1],linewidth=2,color='tab:green')
ax[1].plot(coords_CRATER[:,0],coords_CRATER[:,1],linewidth=2,color='black',linestyle='--')

In [ ]:
plt.close(all)

In [13]:
%matplotlib osx

# create big figure with all comparison 
grid_size = 1000
clims = ([-3, 3],[-3, 3],[-15, 15],[-1,1])
cmap = cm.vik
lon_lims = [110.4313, 110.4496]
lat_lims = [-7.5463, -7.5350]
big_fig = plt.figure()

big_gs = GridSpec(3, 4, figure=big_fig)
big_ax00 = big_fig.add_subplot(big_gs[0, 0]) # pair 1 win 2 rng pre filt
big_ax01 = big_fig.add_subplot(big_gs[0, 1]) # pair 2 win 2 rng pre filt
big_ax02 = big_fig.add_subplot(big_gs[0, 2]) # pair 3 win 2 rng pre filt
big_ax03 = big_fig.add_subplot(big_gs[0, 3]) # pair 4 win 2 rng pre filt

big_ax10 = big_fig.add_subplot(big_gs[1, 0]) # pair 1 win 2 rng filt
big_ax11 = big_fig.add_subplot(big_gs[1, 1]) # pair 2 win 2 rng filt
big_ax12 = big_fig.add_subplot(big_gs[1, 2]) # pair 3 win 2 rng filt
big_ax13 = big_fig.add_subplot(big_gs[1, 3]) # pair 4 win 2 rng filt

big_ax20 = big_fig.add_subplot(big_gs[2, 0]) # pair 1 win 2 rng mka 1-3
big_ax21 = big_fig.add_subplot(big_gs[2, 1]) # pair 2 win 2 rng mka 1-3
big_ax22 = big_fig.add_subplot(big_gs[2, 2]) # pair 3 win 2 rng mka 1-3
big_ax23 = big_fig.add_subplot(big_gs[2, 3]) # pair 4 win 2 rng mka 1-3




for a in big_fig.axes:
    # a.imshow(SHADING,cmap=cm.grayC,alpha=0.5, extent=DEM_EXTENT)
    a.set_axis_off()
    a.set_xlim(lon_lims)
    a.set_ylim(lat_lims)
    a.set_aspect('equal', 'box')



In [14]:
# add pre filtered data to big fig

# range offset
for i, (a,clim) in enumerate(zip([big_ax00,big_ax01,big_ax02,big_ax03],clims)):
    hex_plot = a.hexbin(example_pairs[i].Stack[1].Lon_off.flatten(),
             example_pairs[i].Stack[1].Lat_off.flatten(),
             C=example_pairs[i].Stack[1].R_off.flatten(),
             gridsize=grid_size,
             cmap=cmap,
             vmin=clim[0],
             vmax=clim[1])
    a.set_xlim(lon_lims)
    a.set_ylim(lat_lims)
    a.set_aspect('equal', 'box')
    a.add_artist(ScaleBar(sm.plot.get_1deg_dist(),location='lower left'))
    a.plot(coords_L1888[:,0],coords_L1888[:,1],linewidth=2,color='tab:blue',label='L1888')
    a.plot(coords_L1948[:,0],coords_L1948[:,1],linewidth=2,color='tab:cyan',label='L1948')
    a.plot(coords_L1956_1[:,0],coords_L1956_1[:,1],linewidth=2,color='tab:red',label='L1956')
    a.plot(coords_L1956_2[:,0],coords_L1956_2[:,1],linewidth=2,color='tab:red')
    a.plot(coords_L1992[:,0],coords_L1992[:,1],linewidth=2,color='tab:purple',label='L1992')
    a.plot(coords_L1997[:,0],coords_L1997[:,1],linewidth=2,color='tab:olive',label='L1997')
    a.plot(coords_L1998[:,0],coords_L1998[:,1],linewidth=2,color='tab:green',label='L1998')
    a.plot(coords_CRATER[:,0],coords_CRATER[:,1],linewidth=2,color='black',linestyle='--',label='Crater rim')
    cax = add_top_cax(a, pad=0.03, height=0.01)
    cbar = big_fig.colorbar(hex_plot,cax= cax, label='Range offset [m]',orientation = 'horizontal', location='top')
# # azimuth offset
# for i, a in enumerate([big_ax30,big_ax31,big_ax32,big_ax33]):
#     a.hexbin(example_pairs[i].Stack[2].Lon_off.flatten(),example_pairs[i].Stack[2].Lat_off.flatten(),C=example_pairs[i].Stack[2].A_off.flatten(),gridsize=grid_size,cmap=cmap,vmin=clims[0],vmax=clims[1])
#     a.set_xlim(lon_lims)
#     a.set_ylim(lat_lims)
#     a.set_aspect('equal', 'box')
#     a.add_artist(ScaleBar(sm.plot.get_1deg_dist(),location='lower left'))



In [15]:
%matplotlib osx
from scipy.ndimage import generic_filter
from skimage.morphology import disk
from skimage import filters
from scipy.spatial import cKDTree

filt_size = 3
filt_radius = 3
footprint = disk(radius=filt_radius)
R_non_veg_list = []
R_veg_list = []
A_non_veg_list = []
A_veg_list = []

for obj in example_pairs[4].Stack:
    R_off = obj.R_off
    A_off = obj.A_off

    print('starting filters')

    R_off_std = generic_filter(R_off, np.nanstd, footprint=footprint)
    A_off_std = generic_filter(A_off, np.nanstd, footprint=footprint)

    print('filters done')


    DEM_lon_lat = np.column_stack((DEM_lons.flatten(),DEM_lats.flatten()))
    NDVI_lon_lat = np.column_stack((NDVI_lons.flatten(),NDVI_lats.flatten()))
    data_lon_lat = np.column_stack((obj.Lon_off.flatten(),obj.Lat_off.flatten()))

    print('build trees')
    kdtree_dem = cKDTree(DEM_lon_lat)
    kdtree_ndvi = cKDTree(NDVI_lon_lat)
    print('done building trees')

    data_dem = np.empty(np.shape(R_off.flatten()))
    data_slope = np.empty(np.shape(R_off.flatten()))
    data_ndvi = np.empty(np.shape(R_off.flatten()))
    idx_list = []
    for i, point in enumerate(data_lon_lat):
        if not all(np.isnan(point)):
            print(i)
            distance,index_DEM = kdtree_dem.query(point)
            distance,index_NDVI = kdtree_ndvi.query(point)
            idx_list.append([i,index_DEM,index_NDVI])

    idx_list = np.asarray(idx_list)
    data_dem[idx_list[:,0]] = DEM_heights.flatten()[idx_list[:,1]]
    data_slope[idx_list[:,0]] = DEM_slope.flatten()[idx_list[:,1]]
    data_ndvi[idx_list[:,0]] = NDVI.flatten()[idx_list[:,2]]
    data_ndvi[data_ndvi<-1] = np.nan

    R_sel_non_veg = R_off_std.flatten()[np.argwhere(np.abs(data_ndvi) <= 0.1)]
    A_sel_non_veg = A_off_std.flatten()[np.argwhere(np.abs(data_ndvi) <= 0.1)]
    R_sel_veg = R_off_std.flatten()[np.argwhere(data_ndvi >= 0.5)]
    A_sel_veg = A_off_std.flatten()[np.argwhere(data_ndvi >= 0.5)]

    R_data_non_veg = R_sel_non_veg.flatten()
    R_data_veg = R_sel_veg.flatten()
    R_data_non_veg[R_data_non_veg <= 0] = np.nan
    R_data_veg[R_data_veg <= 0] = np.nan
    A_data_non_veg = A_sel_non_veg.flatten()
    A_data_veg = A_sel_veg.flatten()
    A_data_non_veg[A_data_non_veg <= 0] = np.nan
    A_data_veg[A_data_veg <= 0] = np.nan

    R_non_veg_list.append(R_data_non_veg)
    R_veg_list.append(R_data_veg)
    A_non_veg_list.append(A_data_non_veg)
    A_veg_list.append(A_data_veg)


starting filters


/Users/tz20896/anaconda3/envs/PhD_clean/lib/python3.8/site-packages/numpy/lib/nanfunctions.py:1872: RuntimeWarning: Degrees of freedom <= 0 for slice.
  var = nanvar(a, axis=axis, dtype=dtype, out=out, ddof=ddof,


filters done


NameError: name 'DEM_lons' is not defined

In [10]:
print(dir(example_pairs[0]))


['A_win', 'Ccs_maps', 'Data', 'Data_ccs', 'Date1', 'Date2', 'Filenames', 'Filenames_ccs', 'Heading', 'Lat', 'Lat_file', 'Lat_vec', 'Limits', 'Lon', 'Lon_file', 'Lon_vec', 'Mask_data', 'Mask_data_ccs', 'Mean_inc', 'R_win', 'Run_MKA', 'Run_RSS', 'Stack', '__class__', '__delattr__', '__dict__', '__dir__', '__doc__', '__eq__', '__format__', '__ge__', '__getattribute__', '__gt__', '__hash__', '__init__', '__init_subclass__', '__le__', '__lt__', '__module__', '__ne__', '__new__', '__reduce__', '__reduce_ex__', '__repr__', '__setattr__', '__sizeof__', '__str__', '__subclasshook__', '__weakref__', 'add_lat_lon_to_data', 'assign_data_to_stack', 'crop_stack_ccs', 'get_latlon_from_file', 'get_params_from_file_name', 'query_point_MKA', 'query_point_stack']


In [18]:
import h5py
# write results to csv file:
# column_names = ['win_1_Lon', 'win_1_lat', 'win_1_R_off', 'win_1_A_off',
#                 'win_2_Lon', 'win_2_lat', 'win_2_R_off', 'win_2_A_off',
#                 'win_3_Lon', 'win_3_lat', 'win_3_R_off', 'win_3_A_off',
#                 'win_4_Lon', 'win_4_lat', 'win_4_R_off', 'win_4_A_off',
#                 'win_5_Lon', 'win_5_lat', 'win_5_R_off', 'win_5_A_off',
#                 'win_13_Lon', 'win_13_lat', 'win_13_R_off', 'win_13_A_off',
#                 'win_15_Lon', 'win_15_lat', 'win_15_R_off', 'win_15_A_off',]

# attr_names = ['Lon_off','Lat_off','R_off','A_off',
#               'Lon_off','Lat_off','R_off','A_off',
#               'Lon_off','Lat_off','R_off','A_off',
#               'Lon_off','Lat_off','R_off','A_off',
#               'Lon_off','Lat_off','R_off','A_off',
#               'Lon_off_MKA','Lat_off_MKA','MKA_R_off','MKA_A_off',
#               'Lon_off_MKA','Lat_off_MKA','MKA_R_off','MKA_A_off',]

column_names = ['win_1_Lon_pre', 'win_1_lat_pre', 'win_1_R_off_pre', 'win_1_A_off_pre',
                'win_2_Lon_pre', 'win_2_lat_pre', 'win_2_R_off_pre', 'win_2_A_off_pre',
                'win_3_Lon_pre', 'win_3_lat_pre', 'win_3_R_off_pre', 'win_3_A_off_pre',
                'win_4_Lon_pre', 'win_4_lat_pre', 'win_4_R_off_pre', 'win_4_A_off_pre',
                'win_5_Lon_pre', 'win_5_lat_pre', 'win_5_R_off_pre', 'win_5_A_off_pre',
]

attr_names = ['Lon_off','Lat_off','R_off','A_off',
              'Lon_off','Lat_off','R_off','A_off',
              'Lon_off','Lat_off','R_off','A_off',
              'Lon_off','Lat_off','R_off','A_off',
              'Lon_off','Lat_off','R_off','A_off',
]
  
  
add_ons = ['v3', 'v3', 'v3', 'v3']         
for i, (pair, add_on) in enumerate(zip(example_pairs,add_ons)):
    objs = [] 
    name = pair.Filenames[0][0:19]  
    print(name)
    for obj in pair.Stack:
        objs.append(obj)

    # objs.append(pair)  
    # objs.append(MKA_data_list_list[i][0])  
    # objs.append(MKA_data_list_list[i][0])  
    # objs.append(MKA_data_list_list[i][1])  

    for i, obj in enumerate(objs):
        print(obj)
        f = h5py.File(f'/Users/tz20896/Documents/PhD/projects/SPOTSAR/test_data/CSK_dsc/filtered_MKA_offsets/{name}_{add_on}.h5','a')
        f.create_dataset(column_names[0 + i*4], data = getattr(obj,attr_names[0 + i*4]))
        f.create_dataset(column_names[1 + i*4], data = getattr(obj,attr_names[1 + i*4]))
        f.create_dataset(column_names[2 + i*4], data = getattr(obj,attr_names[2 + i*4]))
        f.create_dataset(column_names[3 + i*4], data = getattr(obj,attr_names[3 + i*4]))
        f.close()
    #     df[column_names[0 + i*4]] = getattr(obj,attr_names[0 + i*4])
    #     df[column_names[1 + i*4]] = getattr(obj,attr_names[1 + i*4])
    #     df[column_names[2 + i*4]] = getattr(obj,attr_names[2 + i*4])
    #     df[column_names[3 + i*4]] = getattr(obj,attr_names[3 + i*4])
    # df.to_csv(f'/Users/markbemelmans/Documents/PhD/projects/SPOTSAR/test_data/CSK_dsc/filtered_MKA_offsets/{name}.csv')




c20200927_c20201113


ValueError: Unable to create dataset (name already exists)

In [19]:
## sequential median (0.9) then 

cut_off_med = 0.9

for i in range(len(example_pairs[0:-1])):
    for obj in example_pairs[i].Stack:
        print(obj)
        obj.rem_outliers_median(7,cut_off_med)
        obj.reset_vecs()



In [20]:
# add filtered data to big fig

# range offset
for i, (a, clim) in enumerate(zip([big_ax10,big_ax11,big_ax12,big_ax13],clims)):
    a.hexbin(example_pairs[i].Stack[1].Lon_off.flatten(),
             example_pairs[i].Stack[1].Lat_off.flatten(),
             C=example_pairs[i].Stack[1].R_off.flatten(),
             gridsize=grid_size,
             cmap=cmap,
             vmin=clim[0],
             vmax=clim[1])
    a.set_xlim(lon_lims)
    a.set_ylim(lat_lims)
    a.set_aspect('equal', 'box')
    a.add_artist(ScaleBar(sm.plot.get_1deg_dist(),location='lower left'))
    a.plot(coords_L1888[:,0],coords_L1888[:,1],linewidth=2,color='tab:blue',label='L1888')
    a.plot(coords_L1948[:,0],coords_L1948[:,1],linewidth=2,color='tab:cyan',label='L1948')
    a.plot(coords_L1956_1[:,0],coords_L1956_1[:,1],linewidth=2,color='tab:red',label='L1956')
    a.plot(coords_L1956_2[:,0],coords_L1956_2[:,1],linewidth=2,color='tab:red')
    a.plot(coords_L1992[:,0],coords_L1992[:,1],linewidth=2,color='tab:purple',label='L1992')
    a.plot(coords_L1997[:,0],coords_L1997[:,1],linewidth=2,color='tab:olive',label='L1997')
    a.plot(coords_L1998[:,0],coords_L1998[:,1],linewidth=2,color='tab:green',label='L1998')
    a.plot(coords_CRATER[:,0],coords_CRATER[:,1],linewidth=2,color='black',linestyle='--',label='Crater rim')


# # azimuth offset
# for i, a in enumerate([big_ax40,big_ax41,big_ax42,big_ax43]):
#     a.hexbin(example_pairs[i].Stack[2].Lon_off.flatten(),example_pairs[i].Stack[2].Lat_off.flatten(),C=example_pairs[i].Stack[2].A_off.flatten(),gridsize=grid_size,cmap=cmap,vmin=clims[0],vmax=clims[1])
#     a.set_xlim(lon_lims)
#     a.set_ylim(lat_lims)
#     a.set_aspect('equal', 'box')
#     a.add_artist(ScaleBar(sm.plot.get_1deg_dist(),location='lower left'))

In [ ]:
## plot outlier removed maps
lon_lims = [110.428, 110.45]
lat_lims = [-7.550, -7.528]
fig, ax = plot_ra_offsets(example_pairs[0].Stack[4],SHADING,DEM_EXTENT,[-3,3],500,lat_lims=lat_lims,lon_lims=lon_lims,cmap=cm.vik)
ax[0].set_axis_off()
ax[1].set_axis_off()
ax[0].plot(coords_L1888[:,0],coords_L1888[:,1],linewidth=2,color='tab:blue',label='L1888')
ax[0].plot(coords_L1992[:,0],coords_L1992[:,1],linewidth=2,color='tab:pink',label='L1992')
ax[0].plot(coords_L1998[:,0],coords_L1998[:,1],linewidth=2,color='tab:green',label='L1998')
ax[0].plot(coords_CRATER[:,0],coords_CRATER[:,1],linewidth=2,color='black',linestyle='--',label='Crater rim')
ax[1].plot(coords_L1888[:,0],coords_L1888[:,1],linewidth=2,color='tab:blue')
ax[1].plot(coords_L1992[:,0],coords_L1992[:,1],linewidth=2,color='tab:pink')
ax[1].plot(coords_L1998[:,0],coords_L1998[:,1],linewidth=2,color='tab:green')
ax[1].plot(coords_CRATER[:,0],coords_CRATER[:,1],linewidth=2,color='black',linestyle='--')

In [21]:
def Run_MKA(q_obj,indeces=[],window_size=1,comp_lim=0.5,CI_lim=5):
        # """
        # Run Multi-kernel averaging where user can define seleced indices from the stack, 
        # desired window size, and a completion factor as a high pass filter

        # Args:
        #     indices (list, optional): indices of slices from datastack used for MKA. Defaults to [], use all data.
        #     window_size (int, optional): window dimension for MKA, odd numbers 
        #                                  prefered because of pixel centering. 
        #                                  Defaults to 1.
        #     comp_lim (float, optional): completion limit between [0.0, 1.0]
        #                                 Only take data for MKA if more than 
        #                                 comp_lim of the stack is not nan. 
        #                                 Defaults to 0.5.

        # Returns:
        #     avg_map: Multi-kernel Average map
        # """
        # get stack data
        if indeces==[]:
            stack_R = [obj.R_off for obj in q_obj.Stack]
            stack_A = [obj.A_off for obj in q_obj.Stack]
            stack_ccp = [obj.Ccp_off for obj in q_obj.Stack]
            stack_ccs = [obj.Ccs_off for obj in q_obj.Stack]
        else:
            substack = [q_obj.Stack[i] for i in indeces]
            stack_R = np.stack([obj.R_off for obj in substack],axis=0)
            stack_A = np.stack([obj.A_off for obj in substack],axis=0)
            stack_ccp = np.stack([obj.Ccp_off for obj in substack],axis=0)
            stack_ccs = np.stack([obj.Ccs_off for obj in substack],axis=0)

        # create list of maps to make 
        avg_maps = []
        offset = window_size // 2

        for stack in [stack_R,stack_A]:
            # set window size according to stack dimensions
            window_shape = (stack.shape[0], window_size, window_size)
            print(np.shape(window_shape))
            # define shape of multi-kernel averaged map (same as input data), filled with nan
            Avg_map = np.full(stack.shape[1:], np.nan)

            # mean_map = np.nanmean(stack,axis=0)
            # print(np.shape(mean_map))
            # for i in range(mean_map.shape[0]):
            #     for j in range(mean_map.shape[1]):
            #         Avg_map[i + offset,j + offset] = mean_map[i,j]
            
            # use np.lib.stride_tricks.sliding_window_view to devided data into windows
            # 1.2xfaster than sklearn view_as_windows
            win_data = np.lib.stride_tricks.sliding_window_view(stack, window_shape)[0]



            # remove data that is nan for too many different window sizes
            nan_frac = np.sum(np.isnan(win_data), axis=2) / (window_size ** 2)
            nan_frac = nan_frac/np.shape(win_data)[2]
            nan_frac[nan_frac > comp_lim] = np.nan
            nan_frac[nan_frac <= comp_lim] = 1
            win_data = np.multiply(win_data, nan_frac[..., np.newaxis])

            # # define shape of multi-kernel averaged map (same as input data), filled with nan
            Avg_map = np.full(stack.shape[1:], np.nan)

            # per window, go take 95% confidence interval data and take average (mean)
            for win_i in range(win_data.shape[0]):
                if win_i % 50 == 2:
                    print('win_i', win_i)
                    print('win',win.flatten(),'mean',np.nanmean(win), 'z_score',z_score.flatten())
                for win_j in range(win_data.shape[1]):
                    offset = window_size // 2
                    # extract relevant window
                    win = win_data[win_i, win_j]
                    # calculate 95 % confidence interval
                    # Avg_map[win_i + offset, win_j + offset] = np.nanmean(win)
                    
                    if np.sum(~np.isnan(win))==1:
                         Avg_map[win_i + offset, win_j + offset] = np.nanmean(win)
                    elif CI_lim == 0:
                         Avg_map[win_i + offset, win_j + offset] = np.nanmean(win)
                    else:
                        # percentiles = np.nanpercentile(win, [CI_lim/2, 100-(CI_lim/2)])
                        # # mask data outside 95% confidence interval with nan
                        # mask = (win < percentiles[0]) | (win > percentiles[1])
                        # win[mask] = np.nan
                        # # calculate mean of window (offset by floor(window_size/2) because of border)
                        
                        # Avg_map[win_i + offset, win_j + offset] = np.nanmean(win)
                        data_std = np.nanstd(win)
                        data_mean = np.nanmean(win)
                        z_score = (win-data_mean)/data_std
                        mask = np.abs(z_score) > 1 # 95 conf interval
                        win[mask] = np.nan
                        Avg_map[win_i + offset, win_j + offset] = np.nanmean(win)


            avg_maps.append(Avg_map)
        q_obj.MKA_R_off = avg_maps[0]
        q_obj.MKA_A_off = avg_maps[1]
        # stack_obj.MKA_Ccp_off = avg_maps[2]
        # stack_obj.MKA_Ccs_off = avg_maps[3]

        return q_obj.MKA_R_off, q_obj.MKA_A_off

In [ ]:
# def Run_MKA2(q_obj, indeces=[], window_size=1, comp_lim=0.5, CI_lim=5):
#     if indeces == []:
#         stack_R = np.stack([obj.R_off for obj in q_obj.Stack], axis=0)
#         stack_A = np.stack([obj.A_off for obj in q_obj.Stack], axis=0)
#     else:
#         substack = [q_obj.Stack[i] for i in indeces]
#         stack_R = np.stack([obj.R_off for obj in substack], axis=0)
#         stack_A = np.stack([obj.A_off for obj in substack], axis=0)

#     window_size_half = window_size // 2
#     nan_frac_indices = np.shape(stack_R)[2]

#     avg_maps = []

#     for stack in [stack_R, stack_A]:
#         window_shape = (stack.shape[0], window_size, window_size)
#         win_data = np.lib.stride_tricks.sliding_window_view(stack, window_shape)[0]

#         nan_frac = np.sum(np.isnan(win_data), axis=2) / (window_size ** 2)
#         nan_frac /= nan_frac_indices
#         nan_frac = np.where(nan_frac > comp_lim, np.nan, 1)
#         win_data = win_data * nan_frac[..., np.newaxis]

#         Avg_map = np.full(stack.shape[1:], np.nan)

#         for win_i in range(win_data.shape[0]):
#             offset_i = win_i + window_size_half
#             if offset_i % 50 == 0:
#                 print('win_i', offset_i)

#             win = win_data[win_i]

#             if np.sum(~np.isnan(win))==1 or CI_lim == 0:
#                 Avg_map[offset_i, window_size_half:-(window_size_half)] = np.nanmean(win, axis=0).reshape(-1)
#             else:
#                 percentiles = np.nanpercentile(win, [CI_lim/2, 100-(CI_lim/2)], axis=0)
#                 mask = (win < percentiles[0]) | (win > percentiles[1])
#                 win[mask] = np.nan
#                 Avg_map[offset_i, window_size_half:-(window_size_half)] = np.nanmean(win, axis=0).reshape(-1)

#         avg_maps.append(Avg_map)

#     q_obj.MKA_R_off = avg_maps[0]
#     q_obj.MKA_A_off = avg_maps[1]

#     return q_obj.MKA_R_off, q_obj.MKA_A_off

In [22]:
# get MKA vec data

def get_MKA_vec(obj):
    # Lon_off = getattr(obj.Stack[2],'Lon_off')
    # Lat_off = getattr(obj.Stack[2],'Lat_off')

    rng = np.linspace(obj.Limits[0],obj.Limits[1],int((obj.Limits[1]-obj.Limits[0])/R_STEP)+1)
    azi = np.linspace(obj.Limits[2],obj.Limits[3],int((obj.Limits[3]-obj.Limits[2])/A_STEP)+1)
    RNG, AZI = np.meshgrid(rng,azi)

    Lat_off = np.full(np.shape(RNG)[::-1], np.nan)
    Lon_off = np.full(np.shape(RNG)[::-1], np.nan)
    # find number of range estimates
    for d in obj.Mask_data:
        # fill arrays form indexes 
        Lat_off[d[11],d[12]] = d[9]
        Lon_off[d[11],d[12]] = d[10]
    setattr(obj,'Lon_off_MKA',Lon_off)
    setattr(obj,'Lat_off_MKA',Lat_off)
    
    nan_mask = np.isnan(obj.MKA_R_off)
    MKA_R_off_vec = obj.MKA_R_off[~nan_mask].ravel()
    MKA_A_off_vec = obj.MKA_A_off[~nan_mask].ravel()
    Lon_off_MKA_vec = obj.Lon_off_MKA[~nan_mask].ravel()
    Lat_off_MKA_vec = obj.Lat_off_MKA[~nan_mask].ravel()

    # set attributes
    setattr(obj,'MKA_R_off_vec', MKA_R_off_vec)
    setattr(obj,'MKA_A_off_vec', MKA_A_off_vec)
    setattr(obj,'Lon_off_MKA_vec', Lon_off_MKA_vec)
    setattr(obj,'Lat_off_MKA_vec', Lat_off_MKA_vec)

    # get map data
    MKA_R_off = obj.MKA_R_off
    MKA_A_off = obj.MKA_A_off
    Lon_off_MKA = obj.Lon_off_MKA
    Lat_off_MKA = obj.Lat_off_MKA

    return MKA_R_off_vec, MKA_A_off_vec, Lon_off_MKA_vec, Lat_off_MKA_vec, MKA_R_off, MKA_A_off, Lon_off_MKA, Lat_off_MKA

In [23]:
class MKA_data:

    def __init__(self,mka_R_off_vec, mka_A_off_vec, lon_off_MKA_vec, lat_off_MKA_vec, mka_R_off, mka_A_off, lon_off_MKA, lat_off_MKA):
        self.MKA_R_off_vec = mka_R_off_vec
        self.MKA_A_off_vec = mka_A_off_vec
        self.Lon_off_MKA_vec = lon_off_MKA_vec
        self.Lat_off_MKA_vec = lat_off_MKA_vec
        self.MKA_R_off = mka_R_off
        self.MKA_A_off = mka_A_off
        self.Lon_off_MKA = lon_off_MKA
        self.Lat_off_MKA = lat_off_MKA

In [24]:

MKA_data_list_list = []
idx_test = [0,1,2,3]
for i in idx_test:
    MKA_data_list = []
    obj = example_pairs[i]
    indeces = [0,1,2,3,4]
    MKA_R_off, MKA_A_off = Run_MKA(obj,indeces,1,1,5)
    MKA_R_off_vec, MKA_A_off_vec, Lon_off_MKA_vec, Lat_off_MKA_vec, MKA_R_off, MKA_A_off, Lon_off_MKA, Lat_off_MKA = get_MKA_vec(obj)
    MKA_data_list.append(MKA_data(MKA_R_off_vec, MKA_A_off_vec, Lon_off_MKA_vec, Lat_off_MKA_vec, MKA_R_off, MKA_A_off, Lon_off_MKA, Lat_off_MKA))
    indeces = [0,1,2]
    MKA_R_off, MKA_A_off = Run_MKA(obj,indeces,1,1,1)
    MKA_R_off_vec, MKA_A_off_vec, Lon_off_MKA_vec, Lat_off_MKA_vec, MKA_R_off, MKA_A_off, Lon_off_MKA, Lat_off_MKA = get_MKA_vec(obj)
    MKA_data_list.append(MKA_data(MKA_R_off_vec, MKA_A_off_vec, Lon_off_MKA_vec, Lat_off_MKA_vec, MKA_R_off, MKA_A_off, Lon_off_MKA, Lat_off_MKA))
    MKA_data_list_list.append(MKA_data_list)



(3,)


/var/folders/7b/9xvft5dd0455jpkm_r7rgr3w0000gp/T/ipykernel_15669/3622963870.py:90: RuntimeWarning: Mean of empty slice
  data_mean = np.nanmean(win)
/var/folders/7b/9xvft5dd0455jpkm_r7rgr3w0000gp/T/ipykernel_15669/3622963870.py:94: RuntimeWarning: Mean of empty slice
  Avg_map[win_i + offset, win_j + offset] = np.nanmean(win)


win_i 2
win [  nan 1.341   nan 0.484   nan] mean 0.9125 z_score [        nan  0.70021245  1.22000693 -0.66206239 -1.25815699]


/var/folders/7b/9xvft5dd0455jpkm_r7rgr3w0000gp/T/ipykernel_15669/3622963870.py:91: RuntimeWarning: invalid value encountered in divide
  z_score = (win-data_mean)/data_std


win_i 52
win [   nan -0.012    nan -0.087 -0.067] mean -0.055333333333333325 z_score [-1.27467681  0.82263488  1.45386461 -0.70453383 -0.29728884]
win_i 102
win [   nan -0.059 -0.098 -0.099 -0.125] mean -0.09525 z_score [-1.95625299  0.84685422  0.46192048  0.45205039  0.1954279 ]
win_i 152
win [nan nan nan nan nan] mean nan z_score [nan nan nan nan nan]


/var/folders/7b/9xvft5dd0455jpkm_r7rgr3w0000gp/T/ipykernel_15669/3622963870.py:69: RuntimeWarning: Mean of empty slice
  print('win',win.flatten(),'mean',np.nanmean(win), 'z_score',z_score.flatten())


win_i 202
win [   nan -0.137 -0.136 -0.161 -0.154] mean -0.14700000000000002 z_score [ 1.98470017 -0.36829488 -0.35550686 -0.67520727 -0.58569116]
win_i 252
win [-0.125    nan    nan -0.157 -0.142] mean -0.14133333333333334 z_score [ 0.99843413         nan -1.64569487  0.11705779  0.53020295]
win_i 302
win [   nan -0.03     nan -0.183 -0.03 ] mean -0.081 z_score [        nan  0.9169493  -1.48122579 -0.35267281  0.9169493 ]
win_i 352
win [  nan   nan 0.166 0.179 0.136] mean 0.16033333333333333 z_score [        nan -1.66045677  0.656884    0.89409211  0.10948067]
win_i 402
win [   nan  0.048  0.005 -0.018 -0.022] mean 0.003250000000000001 z_score [-1.95788039  0.85667524  0.50383008  0.31509894  0.28227613]
(3,)
win_i 2
win [   nan    nan    nan  0.215 -0.059] mean 0.078 z_score [        nan  1.20194437 -1.57047828  0.28678299  0.08175092]
win_i 52
win [  nan 0.901 0.87    nan   nan] mean 0.8855 z_score [ 1.02003547  0.73772263  0.67384162 -1.26525612 -1.16634359]
win_i 102
win [   nan  

In [ ]:
print(MKA_data_list_list[4][0])

In [ ]:
f.close()

In [11]:
import h5py
# write results to csv file:
column_names = ['win_1_Lon', 'win_1_lat', 'win_1_R_off', 'win_1_A_off',
                'win_2_Lon', 'win_2_lat', 'win_2_R_off', 'win_2_A_off',
                'win_3_Lon', 'win_3_lat', 'win_3_R_off', 'win_3_A_off',
                'win_4_Lon', 'win_4_lat', 'win_4_R_off', 'win_4_A_off',
                'win_5_Lon', 'win_5_lat', 'win_5_R_off', 'win_5_A_off',
                'win_13_Lon', 'win_13_lat', 'win_13_R_off', 'win_13_A_off',
                'win_15_Lon', 'win_15_lat', 'win_15_R_off', 'win_15_A_off',]

attr_names = ['Lon_off','Lat_off','R_off','A_off',
              'Lon_off','Lat_off','R_off','A_off',
              'Lon_off','Lat_off','R_off','A_off',
              'Lon_off','Lat_off','R_off','A_off',
              'Lon_off','Lat_off','R_off','A_off',
              'Lon_off_MKA','Lat_off_MKA','MKA_R_off','MKA_A_off',
              'Lon_off_MKA','Lat_off_MKA','MKA_R_off','MKA_A_off',]

# column_names = ['win_1_Lon', 'win_1_lat', 'win_1_R_off', 'win_1_A_off',
#                 'win_2_Lon', 'win_2_lat', 'win_2_R_off', 'win_2_A_off',
#                 'win_3_Lon', 'win_3_lat', 'win_3_R_off', 'win_3_A_off',
#                 'win_4_Lon', 'win_4_lat', 'win_4_R_off', 'win_4_A_off',
#                 'win_5_Lon', 'win_5_lat', 'win_5_R_off', 'win_5_A_off',
#                 'win_15_Lon', 'win_15_lat', 'win_15_R_off', 'win_15_A_off',]

# attr_names = ['Lon_off','Lat_off','R_off','A_off',
#               'Lon_off','Lat_off','R_off','A_off',
#               'Lon_off','Lat_off','R_off','A_off',
#               'Lon_off','Lat_off','R_off','A_off',
#               'Lon_off','Lat_off','R_off','A_off',
#               'Lon_off_MKA','Lat_off_MKA','MKA_R_off','MKA_A_off',]
  
  
add_ons = ['v3', 'v3', 'v3', 'v3']         
for i, (pair, add_on) in enumerate(zip(example_pairs,add_ons)):
    objs = [] 
    name = pair.Filenames[0][0:19]  
    print(name)
    for obj in pair.Stack:
        objs.append(obj)

    # objs.append(pair)  
    # objs.append(MKA_data_list_list[i][0])  
    objs.append(MKA_data_list_list[i][0])  
    objs.append(MKA_data_list_list[i][1])  

    for i, obj in enumerate(objs):
        print(obj)
        f = h5py.File(f'/Users/tz20896/Documents/PhD/projects/SPOTSAR/test_data/CSK_dsc/filtered_MKA_offsets/{name}_{add_on}.h5','a')
        f.create_dataset(column_names[0 + i*4], data = getattr(obj,attr_names[0 + i*4]))
        f.create_dataset(column_names[1 + i*4], data = getattr(obj,attr_names[1 + i*4]))
        f.create_dataset(column_names[2 + i*4], data = getattr(obj,attr_names[2 + i*4]))
        f.create_dataset(column_names[3 + i*4], data = getattr(obj,attr_names[3 + i*4]))
        f.close()
    #     df[column_names[0 + i*4]] = getattr(obj,attr_names[0 + i*4])
    #     df[column_names[1 + i*4]] = getattr(obj,attr_names[1 + i*4])
    #     df[column_names[2 + i*4]] = getattr(obj,attr_names[2 + i*4])
    #     df[column_names[3 + i*4]] = getattr(obj,attr_names[3 + i*4])
    # df.to_csv(f'/Users/markbemelmans/Documents/PhD/projects/SPOTSAR/test_data/CSK_dsc/filtered_MKA_offsets/{name}.csv')




c20200927_c20201113


NameError: name 'MKA_data_list_list' is not defined

In [26]:
# load med filt and MKA results from h5 files

import h5py 

# file1 contains window sizes 58, 140, 224, 306, 388, MKA 1-5, MKA 1-3
file1 = '../test_data/CSK_dsc/filtered_MKA_offsets/c20200927_c20201113_v3.h5'
file1 = '../test_data/CSK_dsc/filtered_MKA_offsets/c20210217_c20210218_v3.h5'

# file2 contains window sizes 58, 99, 140, 182, 224, MKA 1-5
file2 = '../test_data/CSK_dsc/filtered_MKA_offsets/c20210217_c20210218_v4.h5'
file2 = '../test_data/CSK_dsc/filtered_MKA_offsets/c20210217_c20210218_v4.h5'

# provide attribute names
attr_names1 = ['win_1_Lon', 'win_1_lat', 'win_1_R_off', 'win_1_A_off',
               'win_2_Lon', 'win_2_lat', 'win_2_R_off', 'win_2_A_off',
               'win_3_Lon', 'win_3_lat', 'win_3_R_off', 'win_3_A_off',
               'win_4_Lon', 'win_4_lat', 'win_4_R_off', 'win_4_A_off',
               'win_5_Lon', 'win_5_lat', 'win_5_R_off', 'win_5_A_off',
               'win_13_Lon', 'win_13_lat', 'win_13_R_off', 'win_13_A_off',
               'win_15_Lon', 'win_15_lat', 'win_15_R_off', 'win_15_A_off',]

attr_names2 = ['win_1_Lon', 'win_1_lat', 'win_1_R_off', 'win_1_A_off',
               'win_2_Lon', 'win_2_lat', 'win_2_R_off', 'win_2_A_off',
               'win_3_Lon', 'win_3_lat', 'win_3_R_off', 'win_3_A_off',
               'win_4_Lon', 'win_4_lat', 'win_4_R_off', 'win_4_A_off',
               'win_5_Lon', 'win_5_lat', 'win_5_R_off', 'win_5_A_off',
               'win_15_Lon', 'win_15_lat', 'win_15_R_off', 'win_15_A_off',]

# define example objects (both pair 4)
obj1 = example_pairs[3]
obj2 = example_pairs[4]

for i, (file, obj,attr_names) in enumerate(zip([file1],[obj1],[attr_names1])):
    f = h5py.File(file,'r')
    for qkey in attr_names:
        attr = np.array(f[f'{qkey}'][:])
        # attr = f.get(f'{qkey}')
        setattr(obj,f'{qkey}',attr)
    f.close() 

In [17]:
print(dir(obj1))

['A_win', 'Ccs_maps', 'Data', 'Data_ccs', 'Date1', 'Date2', 'Filenames', 'Filenames_ccs', 'Heading', 'Lat', 'Lat_file', 'Lat_vec', 'Limits', 'Lon', 'Lon_file', 'Lon_vec', 'Mask_data', 'Mask_data_ccs', 'Mean_inc', 'R_win', 'Run_MKA', 'Run_RSS', 'Stack', '__class__', '__delattr__', '__dict__', '__dir__', '__doc__', '__eq__', '__format__', '__ge__', '__getattribute__', '__gt__', '__hash__', '__init__', '__init_subclass__', '__le__', '__lt__', '__module__', '__ne__', '__new__', '__reduce__', '__reduce_ex__', '__repr__', '__setattr__', '__sizeof__', '__str__', '__subclasshook__', '__weakref__', 'add_lat_lon_to_data', 'assign_data_to_stack', 'crop_stack_ccs', 'get_latlon_from_file', 'get_params_from_file_name', 'outlier_detection_HDBSCAN_stack', 'outlier_detection_LOF_stack', 'outlier_detection_median_stack', 'query_point_MKA', 'query_point_stack', 'win_13_A_off', 'win_13_Lon', 'win_13_R_off', 'win_13_lat', 'win_15_A_off', 'win_15_Lon', 'win_15_R_off', 'win_15_lat', 'win_1_A_off', 'win_1_Lon

In [27]:
print(MKA_data_list_list[1][0].MKA_R_off_vec)

[-0.09833333 -0.11533333 -0.142      ...  0.218       0.205
  0.158     ]


In [30]:
# add MKA 1-3 results to big fig

# range offset
for i, (a,clim) in enumerate(zip([big_ax20,big_ax21,big_ax22,big_ax23],clims)):
    a.clear()


In [31]:

for i, (a,clim) in enumerate(zip([big_ax20,big_ax21,big_ax22,big_ax23],clims)):    
    a.set_axis_off()
    # a.set_xlim(lon_lims)
    # a.set_ylim(lat_lims)
    # a.set_aspect('equal', 'box')
    hex_plot = a.hexbin(MKA_data_list_list[i][1].Lon_off_MKA_vec,MKA_data_list_list[i][1].Lat_off_MKA_vec,C=MKA_data_list_list[i][1].MKA_R_off_vec,gridsize=grid_size,cmap=cmap,vmin=clim[0],vmax=clim[1])
    a.set_xlim(lon_lims)
    a.set_ylim(lat_lims)
    a.set_aspect('equal', 'box')
    a.add_artist(ScaleBar(sm.plot.get_1deg_dist(),location='lower left'))
    a.plot(coords_L1888[:,0],coords_L1888[:,1],linewidth=2,color='tab:blue',label='L1888')
    a.plot(coords_L1948[:,0],coords_L1948[:,1],linewidth=2,color='tab:cyan',label='L1948')
    a.plot(coords_L1956_1[:,0],coords_L1956_1[:,1],linewidth=2,color='tab:red',label='L1956')
    a.plot(coords_L1956_2[:,0],coords_L1956_2[:,1],linewidth=2,color='tab:red')
    a.plot(coords_L1992[:,0],coords_L1992[:,1],linewidth=2,color='tab:purple',label='L1992')
    a.plot(coords_L1997[:,0],coords_L1997[:,1],linewidth=2,color='tab:olive',label='L1997')
    a.plot(coords_L1998[:,0],coords_L1998[:,1],linewidth=2,color='tab:green',label='L1998')
    a.plot(coords_CRATER[:,0],coords_CRATER[:,1],linewidth=2,color='black',linestyle='--',label='Crater rim')
    # cax = add_bottom_cax(a, height=0.01)
    # cbar = big_fig.colorbar(hex_plot,cax= cax, label='Range offset [m]',orientation = 'horizontal')

# for i, a in enumerate([big_ax50,big_ax51,big_ax52,big_ax53]):
#     a.hexbin(MKA_data_list_list[i][1].Lon_off_MKA_vec,MKA_data_list_list[i][1].Lat_off_MKA_vec,C=MKA_data_list_list[i][1].MKA_A_off_vec,gridsize=grid_size,cmap=cmap,vmin=clims[0],vmax=clims[1])
#     a.set_xlim(lon_lims)
#     a.set_ylim(lat_lims)
#     a.set_aspect('equal', 'box')
#     a.add_artist(ScaleBar(sm.plot.get_1deg_dist(),location='lower left'))

In [23]:
# reset clim for pair 3
big_ax01.get_images().set_clim([-15,15])
big_ax11.get_images().set_clim([-15,15])
big_ax21.get_images().set_clim([-15,15])

AttributeError: 'silent_list' object has no attribute 'set_clim'

1   HIToolbox                           0x00007ff8252b6726 _ZN15MenuBarInstance22EnsureAutoShowObserverEv + 102
2   HIToolbox                           0x00007ff8252b62b8 _ZN15MenuBarInstance14EnableAutoShowEv + 52
3   HIToolbox                           0x00007ff825225cd7 _ZN15MenuBarInstance21UpdateAggregateUIModeE21MenuBarAnimationStylehhh + 1113
4   HIToolbox                           0x00007ff8252b6173 _ZN15MenuBarInstance19SetFullScreenUIModeEjj + 175
5   AppKit                              0x00007ff81ed83287 -[NSApplication _setPresentationOptions:instance:flags:] + 1145
6   AppKit                              0x00007ff81ebd8055 -[NSApplication _updateFullScreenPresentationOptionsForInstance:] + 582
7   AppKit                              0x00007ff81f6267f0 -[_NSFullScreenSpace(PresentationInstance) activateFullScreenPresentationOptions] + 207
8   AppKit                              0x00007ff81f4795d8 -[_NSEnterFullScreenTransitionController _doSucceededToEnterFullScreen] + 721


In [ ]:
# # MKA reuslt
# query points
q1 = [110.446216,-7.536389] # stable no veg north
q2 = [110.42647,-7.53297] # stable veg north west
q3 = [110.4421429,-7.5377992] # L1888
q4 = [110.44214,-7.54237] # L1998 large disp
q5 = [110.44013,-7.54678] # stable no veg south
q6 = [110.44200,-7.53604] # L1956 offset gradient
query_points = np.stack((q1,q2,q3,q4,q5,q6))
r = 50

[q_mean_MKA, q_median_MKA, q_std_MKA, q_95_MKA], coordinate_circles = example_pairs[0].query_point_MKA('MKA_R_off',
                                                                                                 query_points[:,1],
                                                                                                 query_points[:,0],
                                                                                                 r)  
print('\n')
print(f'Range mean for A, B, C: {q_mean_MKA}')
print(f'Range median for A, B, C: {q_median_MKA}')
print(f'Range standard deviation for A, B, C: {q_std_MKA}')
print(f'Range 95\% confidence interval fro A, B, C: {q_95_MKA}')

[q_mean_MKA, q_median_MKA, q_std_MKA, q_95_MKA], coordinate_circles = example_pairs[0].query_point_MKA('MKA_A_off',
                                                                                                 query_points[:,1],
                                                                                                 query_points[:,0],
                                                                                                 r)  
print('\n')
print(f'Azimuth mean for A, B, C: {q_mean_MKA}')
print(f'Azimuth median for A, B, C: {q_median_MKA}')
print(f'Azimuth standard deviation for A, B, C: {q_std_MKA}')
print(f'Azimuth 95\% confidence interval fro A, B, C: {q_95_MKA}')


In [12]:
import fiona
from matplotlib.colors import ListedColormap
from matplotlib import cm as mpl_cm
## find nearest elevation, slope, and NDVI values
DEM_FILE = './test_data/DEM/TDX_Merapi_WGS84_5m.tif'
SLOPE_FILE = './test_data/DEM/TDX_Merapi_WGS84_5m_slope.tif'
NDVI_FILE = '/Users/markbemelmans/Documents/PhD/projects/Merapi2021/sentinel2/Sentinel_NDVI_WGS84_v2.tif'

with rio.open(DEM_FILE) as src:
    DEM_heights = src.read(1)
    print('Band1 has shape', DEM_heights.shape)
    height = DEM_heights.shape[0]
    width = DEM_heights.shape[1]
    cols, rows = np.meshgrid(np.arange(width), np.arange(height))
    xs, ys = rio.transform.xy(src.transform, rows, cols)
    DEM_lons = np.array(xs)
    DEM_lats = np.array(ys)
    DEM_extent = [src.bounds.left,src.bounds.right,src.bounds.bottom,src.bounds.top]

with rio.open(SLOPE_FILE) as src:
    DEM_slope = src.read(1)


# define map region of interest
lon_lims = [np.nanmin(DEM_lons), np.nanmax(DEM_lons)]
lat_lims = [np.nanmin(DEM_lats), np.nanmax(DEM_lats)]
crop_flag=1

# create cropping polygon from ROI
if crop_flag:
    coords = ((lon_lims[0], lat_lims[0]), (lon_lims[0], lat_lims[1]), (lon_lims[1], lat_lims[1]), (lon_lims[1], lat_lims[0]), (lon_lims[0], lat_lims[0]))
    crop_poly = Polygon(coords)
    crop_poly_geojson = gpd.GeoSeries([crop_poly])
    crop_poly_geojson.to_file('./test_data/crop_ndvi_poly.shp',crs="EPSG:4326")


with fiona.open('./test_data/crop_ndvi_poly.shp', "r") as shapefile:
    shapes = [feature["geometry"] for feature in shapefile]

# get data and read coords from first file
with rio.open(NDVI_FILE) as src:
    out_image, out_transform = rasterio.mask.mask(src, shapes, crop=True)
    out_meta = src.meta
    out_meta.update({"driver": "GTiff",
                 "height": out_image.shape[1],
                 "width": out_image.shape[2],
                 "transform": out_transform})
with rasterio.open("./test_Data/ndvi_cropped.tif", "w", **out_meta) as dest:
    dest.write(out_image)

with rio.open("./test_Data/ndvi_cropped.tif") as src:
    NDVI = src.read(1)
    print('Band1 has shape', NDVI.shape)
    height = NDVI.shape[0]
    width = NDVI.shape[1]
    cols, rows = np.meshgrid(np.arange(width), np.arange(height))
    xs, ys = rio.transform.xy(src.transform, rows, cols)
    NDVI_lons = np.array(xs)
    NDVI_lats = np.array(ys)
    NDVI_extent = [src.bounds.left,src.bounds.right,src.bounds.bottom,src.bounds.top]

# define colormaps
x= mpl_cm.get_cmap('Blues_r', 135)
y= mpl_cm.get_cmap('YlGn', 135)
z = np.vstack((x(range(135)),
                       y(range(135))))
ndvi_cmap = ListedColormap(z, name='BlYlGn')

Band1 has shape (2028, 1672)
Band1 has shape (171, 141)


/var/folders/m9/32v45xkn4zx6js6htb1prb2r0000gn/T/ipykernel_90802/3051735146.py:63: MatplotlibDeprecationWarning: The get_cmap function was deprecated in Matplotlib 3.7 and will be removed two minor releases later. Use ``matplotlib.colormaps[name]`` or ``matplotlib.colormaps.get_cmap(obj)`` instead.
  x= mpl_cm.get_cmap('Blues_r', 135)
/var/folders/m9/32v45xkn4zx6js6htb1prb2r0000gn/T/ipykernel_90802/3051735146.py:64: MatplotlibDeprecationWarning: The get_cmap function was deprecated in Matplotlib 3.7 and will be removed two minor releases later. Use ``matplotlib.colormaps[name]`` or ``matplotlib.colormaps.get_cmap(obj)`` instead.
  y= mpl_cm.get_cmap('YlGn', 135)


In [ ]:
%matplotlib osx
from scipy.ndimage import generic_filter
from skimage.morphology import disk
from skimage import filters
from scipy.spatial import cKDTree

filt_size = 3
filt_radius = 3
footprint = disk(radius=filt_radius)
R_non_veg_list = []
R_veg_list = []
A_non_veg_list = []
A_veg_list = []

for obj in example_pairs[3].Stack:
    R_off = obj.R_off
    A_off = obj.A_off

    print('starting filters')

    R_off_std = generic_filter(R_off, np.nanstd, footprint=footprint)
    A_off_std = generic_filter(A_off, np.nanstd, footprint=footprint)

    print('filters done')


    DEM_lon_lat = np.column_stack((DEM_lons.flatten(),DEM_lats.flatten()))
    NDVI_lon_lat = np.column_stack((NDVI_lons.flatten(),NDVI_lats.flatten()))
    data_lon_lat = np.column_stack((obj.Lon_off.flatten(),obj.Lat_off.flatten()))

    print('build trees')
    kdtree_dem = cKDTree(DEM_lon_lat)
    kdtree_ndvi = cKDTree(NDVI_lon_lat)
    print('done building trees')

    data_dem = np.empty(np.shape(R_off.flatten()))
    data_slope = np.empty(np.shape(R_off.flatten()))
    data_ndvi = np.empty(np.shape(R_off.flatten()))
    idx_list = []
    for i, point in enumerate(data_lon_lat):
        if not all(np.isnan(point)):
            print(i)
            distance,index_DEM = kdtree_dem.query(point)
            distance,index_NDVI = kdtree_ndvi.query(point)
            idx_list.append([i,index_DEM,index_NDVI])

    idx_list = np.asarray(idx_list)
    data_dem[idx_list[:,0]] = DEM_heights.flatten()[idx_list[:,1]]
    data_slope[idx_list[:,0]] = DEM_slope.flatten()[idx_list[:,1]]
    data_ndvi[idx_list[:,0]] = NDVI.flatten()[idx_list[:,2]]
    data_ndvi[data_ndvi<-1] = np.nan

    R_sel_non_veg = R_off_std.flatten()[np.argwhere(np.abs(data_ndvi) <= 0.1)]
    A_sel_non_veg = A_off_std.flatten()[np.argwhere(np.abs(data_ndvi) <= 0.1)]
    R_sel_veg = R_off_std.flatten()[np.argwhere(data_ndvi >= 0.5)]
    A_sel_veg = A_off_std.flatten()[np.argwhere(data_ndvi >= 0.5)]

    R_data_non_veg = R_sel_non_veg.flatten()
    R_data_veg = R_sel_veg.flatten()
    R_data_non_veg[R_data_non_veg <= 0] = np.nan
    R_data_veg[R_data_veg <= 0] = np.nan
    A_data_non_veg = A_sel_non_veg.flatten()
    A_data_veg = A_sel_veg.flatten()
    A_data_non_veg[A_data_non_veg <= 0] = np.nan
    A_data_veg[A_data_veg <= 0] = np.nan

    R_non_veg_list.append(R_data_non_veg)
    R_veg_list.append(R_data_veg)
    A_non_veg_list.append(A_data_non_veg)
    A_veg_list.append(A_data_veg)



In [ ]:
filt_size = 3
filt_radius = 3
footprint = disk(radius=filt_radius) 
    
for obj in MKA_data_list_list[3]:
    R_off = obj.MKA_R_off
    A_off = obj.MKA_A_off

    print('starting filters')

    R_off_std = generic_filter(R_off, np.nanstd, footprint=footprint)
    A_off_std = generic_filter(A_off, np.nanstd, footprint=footprint)

    print('filters done')


    DEM_lon_lat = np.column_stack((DEM_lons.flatten(),DEM_lats.flatten()))
    NDVI_lon_lat = np.column_stack((NDVI_lons.flatten(),NDVI_lats.flatten()))
    data_lon_lat = np.column_stack((obj.Lon_off_MKA.flatten(),obj.Lat_off_MKA.flatten()))

    print('build trees')
    kdtree_dem = cKDTree(DEM_lon_lat)
    kdtree_ndvi = cKDTree(NDVI_lon_lat)
    print('done building trees')

    data_dem = np.empty(np.shape(R_off.flatten()))
    data_slope = np.empty(np.shape(R_off.flatten()))
    data_ndvi = np.empty(np.shape(R_off.flatten()))
    idx_list = []
    for i, point in enumerate(data_lon_lat):
        if not all(np.isnan(point)):
            print(i)
            distance,index_DEM = kdtree_dem.query(point)
            distance,index_NDVI = kdtree_ndvi.query(point)
            idx_list.append([i,index_DEM,index_NDVI])

    idx_list = np.asarray(idx_list)
    data_dem[idx_list[:,0]] = DEM_heights.flatten()[idx_list[:,1]]
    data_slope[idx_list[:,0]] = DEM_slope.flatten()[idx_list[:,1]]
    data_ndvi[idx_list[:,0]] = NDVI.flatten()[idx_list[:,2]]
    data_ndvi[data_ndvi<-1] = np.nan

    
    
    R_sel_non_veg = R_off_std.flatten()[np.argwhere(np.abs(data_ndvi) <= 0.1)]
    A_sel_non_veg = A_off_std.flatten()[np.argwhere(np.abs(data_ndvi) <= 0.1)]
    R_sel_veg = R_off_std.flatten()[np.argwhere(data_ndvi >= 0.5)]
    A_sel_veg = A_off_std.flatten()[np.argwhere(data_ndvi >= 0.5)]

    R_data_non_veg = R_sel_non_veg.flatten()
    R_data_veg = R_sel_veg.flatten()
    R_data_non_veg[R_data_non_veg <= 0] = np.nan
    R_data_veg[R_data_veg <= 0] = np.nan
    A_data_non_veg = A_sel_non_veg.flatten()
    A_data_veg = A_sel_veg.flatten()
    A_data_non_veg[A_data_non_veg <= 0] = np.nan
    A_data_veg[A_data_veg <= 0] = np.nan

    R_non_veg_list.append(R_data_non_veg)
    R_veg_list.append(R_data_veg)
    A_non_veg_list.append(A_data_non_veg)
    A_veg_list.append(A_data_veg)

In [ ]:
import matplotlib.pyplot as plt

# Sample data (replace with your actual data)
R_group_A = [
    R_non_veg_list[0][~np.isnan(R_non_veg_list[0])],
    R_non_veg_list[1][~np.isnan(R_non_veg_list[1])],
    R_non_veg_list[2][~np.isnan(R_non_veg_list[2])],
    R_non_veg_list[3][~np.isnan(R_non_veg_list[3])],
    R_non_veg_list[4][~np.isnan(R_non_veg_list[4])],
    R_non_veg_list[5][~np.isnan(R_non_veg_list[5])],
]

R_group_B = [
    R_veg_list[0][~np.isnan(R_veg_list[0])],
    R_veg_list[1][~np.isnan(R_veg_list[1])],
    R_veg_list[2][~np.isnan(R_veg_list[2])],
    R_veg_list[3][~np.isnan(R_veg_list[3])],
    R_veg_list[4][~np.isnan(R_veg_list[4])],
    R_veg_list[5][~np.isnan(R_veg_list[5])],
]

A_group_A = [
    A_non_veg_list[0][~np.isnan(A_non_veg_list[0])],
    A_non_veg_list[1][~np.isnan(A_non_veg_list[1])],
    A_non_veg_list[2][~np.isnan(A_non_veg_list[2])],
    A_non_veg_list[3][~np.isnan(A_non_veg_list[3])],
    A_non_veg_list[4][~np.isnan(A_non_veg_list[4])],
    A_non_veg_list[5][~np.isnan(A_non_veg_list[5])],
]

A_group_B = [
    A_veg_list[0][~np.isnan(A_veg_list[0])],
    A_veg_list[1][~np.isnan(A_veg_list[1])],
    A_veg_list[2][~np.isnan(A_veg_list[2])],
    A_veg_list[3][~np.isnan(A_veg_list[3])],
    A_veg_list[4][~np.isnan(A_veg_list[4])],
    A_veg_list[5][~np.isnan(A_veg_list[5])],
]

# Create subplots for box plots


# Create subplots for box plots
fig, axs = plt.subplots(2, 2, figsize=(10, 10))

# Create box plots for group A
axs[0,0].boxplot(R_group_A, labels=["58", "140", "224", "306", "388","MKA 1-5"],showmeans=True)
axs[0,0].set_title("Range offset non-vegetated")
axs[0,0].set_yscale('log')

# Create box plots for group B
axs[0,1].boxplot(R_group_B, labels=["58", "140", "224", "306", "388","MKA 1-5"],showmeans=True)
axs[0,1].set_title("Range offset vegetated")
axs[0,1].set_yscale('log')

# Create box plots for group A
axs[1,0].boxplot(A_group_A, labels=["28", "68", "108", "148", "188","MKA 1-5"],showmeans=True)
axs[1,0].set_title("Azimuth offset non-vegetated")
axs[1,0].set_yscale('log')

# Create box plots for group B
axs[1,1].boxplot(A_group_B, labels=["28", "68", "108", "148", "188","MKA 1-5"],showmeans=True)
axs[1,1].set_title("Azimuth offset vegetated")
axs[1,1].set_yscale('log')



# Add labels and title to the entire figure
for (a,s,t) in zip(axs.ravel(),[0.34,0.34,0.7,0.7],['A','B','C','D']):
    a.set_xlabel("Window sizes [pixels]")
    a.set_ylabel("Standard deviation [m]")
    a.set_ylim([0.0001,10])
    a.annotate(t, xy=[0.02,0.02], xytext=[0.02,0.02], xycoords='axes fraction')

    right_axis = a.twinx()
    right_axis.set_ylim(a.get_ylim()[0]/s, a.get_ylim()[1]/s)
    right_axis.spines['right'].set_position(('outward', 0))
    right_axis.spines['right'].set_linewidth(0.5)
    right_axis.set_ylabel("Pixel fraction [-]")  # Label for the right axis
    right_axis.set_yscale('log')
    a.set_yscale('log')
fig.tight_layout()
# Display the plot
plt.show()



fig, axs = plt.subplots(2, 2, figsize=(10, 10))

# Create box plots for group A
axs[0,0].scatter(range(6),[np.nansum(i)/np.sum(~np.isnan(i)) for i in R_group_A])
axs[0,0].set_title("Range offset non-vegetated")
# axs[0,0].set_yscale('log')

# Create box plots for group B
axs[0,1].scatter(range(6),[np.nansum(i)/np.sum(~np.isnan(i)) for i in R_group_B])
axs[0,1].set_title("Range offset vegetated")
# axs[0,1].set_yscale('log')

# Create box plots for group A
axs[1,0].scatter(range(6),[np.nansum(i)/np.sum(~np.isnan(i)) for i in A_group_A])
axs[1,0].set_title("Azimuth offset non-vegetated")
# axs[1,0].set_yscale('log')

# Create box plots for group B
axs[1,1].scatter(range(6),[np.nansum(i)/np.sum(~np.isnan(i)) for i in A_group_B])
axs[1,1].set_title("Azimuth offset vegetated")
# axs[1,1].set_yscale('log')


In [15]:
import copy
import matplotlib.pyplot as plt
import numpy as np
from matplotlib_scalebar.scalebar import ScaleBar
from matplotlib.gridspec import GridSpec

from cmcrameri import cm

import pyproj
from pyproj import CRS
def plot_ra_offsets_MKA(obj,MKA_R_off,MKA_A_off,shading,dem_extent,clims,grid_size=1000,lat_lims=[],lon_lims=[],cmap=cm.vik,width=[]):
    # get length of 1 deg. for scalebar
    distance_meters = sm.plot.get_1deg_dist()
        # change limits for nicer plotting
    if width==[]:
        Lon_off = getattr(obj.Stack[0],'Lon_off')
        Lat_off = getattr(obj.Stack[0],'Lat_off')
    else:
        obj.get_latlon_from_file(width)
        obj.add_lat_lon_to_data(R_START,A_START)
        obj.crop_stack_ccs(R_STEP,A_STEP)
    

    rng = np.linspace(obj.Limits[0],obj.Limits[1],int((obj.Limits[1]-obj.Limits[0])/R_STEP)+1)
    azi = np.linspace(obj.Limits[2],obj.Limits[3],int((obj.Limits[3]-obj.Limits[2])/A_STEP)+1)
    RNG, AZI = np.meshgrid(rng,azi)


    # find number of range estimates
    for d in obj.Mask_data:
        Lat_off = np.full(np.shape(RNG)[::-1], np.nan)
        Lon_off = np.full(np.shape(RNG)[::-1], np.nan)

        # fill arrays from indexes 
        Lat_off[d[11],d[12]] = d[9]
        Lon_off[d[11],d[12]] = d[10]

    if lat_lims == []:
        lat_lims = [np.min(Lat_off),np.max(Lat_off)]
    
    if lon_lims == []:
        lon_lims = [np.min(Lon_off),np.max(Lon_off)]

    # plotting
    fig1, axes = plt.subplots(2,1,figsize=(8,8))
    axes[0].imshow(shading,cmap=cm.grayC,alpha=0.5, extent=dem_extent)
    axes[1].imshow(shading,cmap=cm.grayC,alpha=0.5, extent=dem_extent)

    plot_data = axes[0].hexbin(Lon_off.flatten(),Lat_off.flatten(),C=MKA_R_off.flatten(),gridsize=grid_size,cmap=cmap,vmin=clims[0],vmax=clims[1])
    axes[0].set_xlim(lon_lims)
    axes[0].set_ylim(lat_lims)
    axes[0].set_aspect('equal', 'box')
    axes[0].add_artist(ScaleBar(distance_meters,location='lower left'))
    # axes[0].set_axis_off()
    cbar = plt.colorbar(plot_data,ax=axes[0])
    cbar.set_label('Slant range offset [m]')

    plot_data = axes[1].hexbin(Lon_off.flatten(),Lat_off.flatten(),C=MKA_A_off.flatten(),gridsize=grid_size,cmap=cmap,vmin=clims[0],vmax=clims[1])
    axes[1].set_xlim(lon_lims)
    axes[1].set_ylim(lat_lims)
    axes[1].set_aspect('equal', 'box')
    axes[1].add_artist(ScaleBar(distance_meters,location='lower left'))
    # axes[0].set_axis_off()
    cbar = plt.colorbar(plot_data,ax=axes[1])
    cbar.set_label('Azimuth offset [m]')
    return fig1, axes
    

In [26]:
%matplotlib osx
## plot MKA results
lon_lims = [110.428, 110.45]
lat_lims = [-7.550, -7.528]



fig, ax = plot_ra_offsets_MKA(example_pairs[3],example_pairs[3].win_15_R_off,example_pairs[3].win_15_A_off,SHADING,DEM_EXTENT,[-3,3],1000,lat_lims=lat_lims,lon_lims=lon_lims,cmap=cm.vik,width=WIDTH)
ax[0].set_axis_off()
ax[1].set_axis_off()
ax[0].plot(coords_L1888[:,0],coords_L1888[:,1],linewidth=2,color='tab:blue',label='L1888')
ax[0].plot(coords_L1992[:,0],coords_L1992[:,1],linewidth=2,color='tab:pink',label='L1992')
ax[0].plot(coords_L1998[:,0],coords_L1998[:,1],linewidth=2,color='tab:green',label='L1998')
ax[0].plot(coords_CRATER[:,0],coords_CRATER[:,1],linewidth=2,color='black',linestyle='--',label='Crater rim')
ax[1].plot(coords_L1888[:,0],coords_L1888[:,1],linewidth=2,color='tab:blue')
ax[1].plot(coords_L1992[:,0],coords_L1992[:,1],linewidth=2,color='tab:pink')
ax[1].plot(coords_L1998[:,0],coords_L1998[:,1],linewidth=2,color='tab:green')
ax[1].plot(coords_CRATER[:,0],coords_CRATER[:,1],linewidth=2,color='black',linestyle='--')

In [21]:
fig, ax = sm.plot.plot_ra_offsets(example_pairs[0].Stack[1],SHADING,DEM_EXTENT,[-3,3],1000,lat_lims=lat_lims,lon_lims=lon_lims,cmap=cm.vik)
ax[0].set_axis_off()
ax[1].set_axis_off()
ax[0].plot(coords_L1888[:,0],coords_L1888[:,1],linewidth=2,color='tab:blue',label='L1888')
ax[0].plot(coords_L1992[:,0],coords_L1992[:,1],linewidth=2,color='tab:pink',label='L1992')
ax[0].plot(coords_L1998[:,0],coords_L1998[:,1],linewidth=2,color='tab:green',label='L1998')
ax[0].plot(coords_CRATER[:,0],coords_CRATER[:,1],linewidth=2,color='black',linestyle='--',label='Crater rim')
ax[1].plot(coords_L1888[:,0],coords_L1888[:,1],linewidth=2,color='tab:blue')
ax[1].plot(coords_L1992[:,0],coords_L1992[:,1],linewidth=2,color='tab:pink')
ax[1].plot(coords_L1998[:,0],coords_L1998[:,1],linewidth=2,color='tab:green')
ax[1].plot(coords_CRATER[:,0],coords_CRATER[:,1],linewidth=2,color='black',linestyle='--')

TypeError: cannot unpack non-iterable NoneType object

In [1]:
%matplotlib osx
# swath profile simple: 

from functools import partial
from mpl_point_clicker import clicker # for user input from map
from inpoly import inpoly2 # for fast inpolygon checks

from matplotlib.ticker import FormatStrFormatter
from shapely.geometry import Polygon, LineString
# from mpl_interactions import zoom_factory, panhandler


# define variables:

grid_size = 1000
cmap = cm.vik
clims= [-3,3]
lon_lims = [110.428, 110.45]
lat_lims = [-7.550, -7.528]
# create swath profile from user input


def poly_line_buffer_lat_lon(line_coords,width):
    line = LineString(line_coords)
    local_azimuthal_projection = f"+proj=aeqd +R=6371000 +units=m +lat_0={line.coords[0][1]} +lon_0={line.coords[0][0]}"

    wgs84_to_aeqd = partial(
            pyproj.transform,
            pyproj.Proj('+proj=longlat +datum=WGS84 +no_defs'),
            pyproj.Proj(local_azimuthal_projection),
            )

    aeqd_to_wgs84 = partial(
            pyproj.transform,
            pyproj.Proj(local_azimuthal_projection),
            pyproj.Proj('+proj=longlat +datum=WGS84 +no_defs'),
            )
    line_transformed = transform(wgs84_to_aeqd, line)
    buffer_line = line_transformed.buffer(width/2,cap_style=2)# capstyle 2 for flat caps the meet profile (so do not go beyond the line)
    return transform(aeqd_to_wgs84, buffer_line)




fig, ax0 =plt.subplots(constrained_layout=True, figsize=(15,10))
plot_data = ax0.hexbin(example_pairs[0].Stack[0].Lon_off.flatten(),example_pairs[0].Stack[0].Lat_off.flatten(),C=example_pairs[0].win_13_R_off.flatten(),gridsize=grid_size,cmap=cmap,vmin=clims[0],vmax=clims[1])
ax0.set_xlim(lon_lims)
ax0.set_ylim(lat_lims)
ax0.set_aspect('equal', 'box')
ax0.add_artist(ScaleBar(110123.8348,location='lower left'))
ax0.plot(coords_L1888[:,0],coords_L1888[:,1],linewidth=2,color='tab:blue',label='L1888')
ax0.plot(coords_L1992[:,0],coords_L1992[:,1],linewidth=2,color='tab:pink',label='L1992')
ax0.plot(coords_L1998[:,0],coords_L1998[:,1],linewidth=2,color='tab:green',label='L1998')
ax0.plot(coords_CRATER[:,0],coords_CRATER[:,1],linewidth=2,color='black',linestyle='--',label='Crater rim')
ax0.set_axis_off()
# axes[0].set_axis_off()
cbar = plt.colorbar(plot_data,ax=ax0)
cbar.set_label('Slant range offset [m]')
# klicker = clicker(ax0, ["query_point"], markers=["x"], colors='green',markersize=15,markeredgewidth=3,**{"linestyle": "-"})









NameError: name 'cm' is not defined

In [24]:
from shapely.ops import transform

width_swath = 50 # m
mouse_pos = klicker.get_positions()['query_point']
start_base = mouse_pos[-2,:] # starting point for profile baseline
end_base = mouse_pos[-1,:] # end point for profile baseline
print('query line: ', start_base, end_base, '\n width: ' , width_swath, ' m')

# start_base = [110.4405519,-7.5337943] # starting point for profile baseline
# end_base = [110.4442428,-7.5371901] # end point for profile baseline

# get line coords and add buffer
line_coords = np.asarray([start_base,end_base])
buffer_poly = poly_line_buffer_lat_lon(line_coords,width_swath)


# show line with buffer
fig, ax0 =plt.subplots(constrained_layout=True, figsize=(15,10))
plot_data = ax0.hexbin(example_pairs[0].Stack[0].Lon_off.flatten(),example_pairs[0].Stack[0].Lat_off.flatten(),C=example_pairs[0].win_15_A_off.flatten(),gridsize=grid_size,cmap=cmap,vmin=clims[0],vmax=clims[1])
ax0.set_xlim(lon_lims)
ax0.set_ylim(lat_lims)
ax0.set_aspect('equal', 'box')
ax0.add_artist(ScaleBar(110123.8348,location='lower left'))
# axes[0].set_axis_off()
cbar = plt.colorbar(plot_data,ax=ax0)
cbar.set_label('Range offset [m]')
ax0.plot(np.asarray(buffer_poly.exterior.coords)[:,0],np.asarray(buffer_poly.exterior.coords)[:,1])
ax0.plot(np.asarray(line_coords)[:,0],np.asarray(line_coords[:,1]))

query line:  [110.44204906  -7.5358702 ] [110.44102221  -7.53791138] 
 width:  50  m


In [ ]:
plt.close('all')

In [25]:
import contextlib
import shapely
import warnings
from distutils.version import LooseVersion

SHAPELY_GE_20 = str(shapely.__version__) >= LooseVersion("2.0")

try:
    from shapely.errors import ShapelyDeprecationWarning as shapely_warning
except ImportError:
    shapely_warning = None

if shapely_warning is not None and not SHAPELY_GE_20:
    @contextlib.contextmanager
    def ignore_shapely2_warnings():
        with warnings.catch_warnings():
            warnings.filterwarnings("ignore", category=shapely_warning)
            yield
else:
    @contextlib.contextmanager
    def ignore_shapely2_warnings():
        yield

/var/folders/m9/32v45xkn4zx6js6htb1prb2r0000gn/T/ipykernel_39697/451538334.py:6: DeprecationWarning: distutils Version classes are deprecated. Use packaging.version instead.
  SHAPELY_GE_20 = str(shapely.__version__) >= LooseVersion("2.0")


In [37]:
# get all points within polygon
from skspatial.objects import Line as sksline
import scipy.spatial.transform 
line = sksline.from_points(point_a=start_base, point_b=end_base)

def geodetic2enu(lat, lon, alt, lat_org, lon_org, alt_org):
    transformer = pyproj.Transformer.from_crs(
        {"proj":'latlong', "ellps":'WGS84', "datum":'WGS84'},
        {"proj":'geocent', "ellps":'WGS84', "datum":'WGS84'},
        )
    x, y, z = transformer.transform( lon,lat,  alt,radians=False)
    x_org, y_org, z_org = transformer.transform( lon_org,lat_org,  alt_org,radians=False)
    vec=np.array([[ x-x_org, y-y_org, z-z_org]]).T
    
    rot1 =  scipy.spatial.transform.Rotation.from_euler('x', -(90-lat_org), degrees=True).as_matrix()#angle*-1 : left handed *-1
    rot3 =  scipy.spatial.transform.Rotation.from_euler('z', -(90+lon_org), degrees=True).as_matrix()#angle*-1 : left handed *-1
    rotMatrix = rot1.dot(rot3)  
    
    enu = np.squeeze(rotMatrix.dot(vec).T)
    return enu

pair_id = 0
isin_list = []
proj_point_list = []
obj_list = [obj for obj in example_pairs[pair_id].Stack]
obj_list.append(example_pairs[pair_id])
obj_list.append(example_pairs[pair_id])
# obj_list.append(MKA_data_list_list[pair_id][0])
# obj_list.append(MKA_data_list_list[pair_id][1])
print(obj_list)
lon_off_vec_list = ['Lon_off_vec','Lon_off_vec','Lon_off_vec','Lon_off_vec','Lon_off_vec','win_13_Lon','win_15_Lon']
lat_off_vec_list = ['Lat_off_vec','Lat_off_vec','Lat_off_vec','Lat_off_vec','Lat_off_vec','win_13_lat','win_15_lat']
R_off_vec_list = ['R_off_vec','R_off_vec','R_off_vec','R_off_vec','R_off_vec','win_13_R_off','win_15_R_off']
A_off_vec_list = ['A_off_vec','A_off_vec','A_off_vec','A_off_vec','A_off_vec','win_13_A_off','win_15_A_off']
# lon_off_vec_list = ['Lon_off_vec','Lon_off_vec','Lon_off_vec','Lon_off_vec','Lon_off_vec','Lon_off_MKA_vec','Lon_off_MKA_vec']
# lat_off_vec_list = ['Lat_off_vec','Lat_off_vec','Lat_off_vec','Lat_off_vec','Lat_off_vec','Lat_off_MKA_vec','Lat_off_MKA_vec']
# R_off_vec_list = ['R_off_vec','R_off_vec','R_off_vec','R_off_vec','R_off_vec','MKA_R_off_vec','MKA_R_off_vec']
# A_off_vec_list = ['A_off_vec','A_off_vec','A_off_vec','A_off_vec','A_off_vec','MKA_A_off_vec','MKA_A_off_vec']


for obj_id, (obj,lon_off_name,lat_off_name,R_off_name) in enumerate(zip(obj_list,lon_off_vec_list,lat_off_vec_list,A_off_vec_list)):
    if obj_id >4:
        lons = getattr(obj,lon_off_name).flatten()
        lats = getattr(obj,lat_off_name).flatten()
    else:
        lons = getattr(obj,lon_off_name)
        lats = getattr(obj,lat_off_name)
    lon_lat = np.dstack((lons,lats))
    isin, ison = inpoly2(np.squeeze(lon_lat),np.asarray(buffer_poly.exterior.coords))
    print(np.count_nonzero(isin))
    isin_list.append(isin)
    proj_point = np.empty(shape=(np.count_nonzero(isin), 3), dtype=float) # pre-alloc nd-array                                  0)

    with ignore_shapely2_warnings():
        if obj_id >4:
            for p_id, lon_lat_id in enumerate(zip(np.squeeze(lon_lat)[isin,:],getattr(obj,R_off_name).flatten()[isin])):
                point = lon_lat_id[0]
                if np.mod(p_id,1000)==0:
                        print('fraction complete:',p_id/np.count_nonzero(isin)) # progress tracker
                proj_point[p_id,:]=np.append(np.asarray(line.project_point(point)),lon_lat_id[1])
        else:
            for p_id, lon_lat_id in enumerate(zip(np.squeeze(lon_lat)[isin,:],getattr(obj,R_off_name)[isin])):
                point = lon_lat_id[0]
                if np.mod(p_id,1000)==0:
                        print('fraction complete:',p_id/np.count_nonzero(isin)) # progress tracker
                proj_point[p_id,:]=np.append(np.asarray(line.project_point(point)),lon_lat_id[1])
    

    # transform projected points to east,north,(up)
    point_transformed = geodetic2enu(proj_point[:,1],
                                    proj_point[:,0],
                                    np.squeeze(np.zeros((np.count_nonzero(isin),1))).T,
                                    start_base[1],
                                    start_base[0],
                                    0)
    #lon,lat,dist along profile, disp
    proj_point = np.stack((proj_point[:,0], 
                                proj_point[:,1],
                                np.linalg.norm(point_transformed[:,0:2],axis=1),
                                proj_point[:,2])).T
    print(proj_point)
    proj_point = proj_point[~np.isnan(proj_point[:,3])]
    proj_point_list.append(proj_point)
    
# proj_points=line.project_point(point(np.squeeze(lon_lat)[isin,:]))

[<SPOTSAR_main.Post_processing.singlekernel.SingleKernel object at 0x7f819a08a280>, <SPOTSAR_main.Post_processing.singlekernel.SingleKernel object at 0x7f819a08a940>, <SPOTSAR_main.Post_processing.singlekernel.SingleKernel object at 0x7f819a095040>, <SPOTSAR_main.Post_processing.singlekernel.SingleKernel object at 0x7f819a095790>, <SPOTSAR_main.Post_processing.singlekernel.SingleKernel object at 0x7f819a095fa0>, <SPOTSAR_main.Post_processing.multikernel.MultiKernel object at 0x7f81b6908190>, <SPOTSAR_main.Post_processing.multikernel.MultiKernel object at 0x7f81b6908190>]
161
fraction complete: 0.0
[[ 1.10442033e+02 -7.53590280e+00  4.03413717e+00 -5.33000000e-01]
 [ 1.10442000e+02 -7.53596868e+00  1.21876456e+01 -5.64000000e-01]
 [ 1.10441294e+02 -7.53737040e+00  1.85646692e+02 -1.01700000e+00]
 [ 1.10442026e+02 -7.53591512e+00  5.55949422e+00 -6.13000000e-01]
 [ 1.10441991e+02 -7.53598483e+00  1.41862125e+01 -6.10000000e-01]
 [ 1.10441959e+02 -7.53604880e+00  2.21019609e+01 -4.3300000

In [ ]:
print(proj_point_list[2])

fig, ax = plt.subplots(1,1)

ax.scatter(proj_point_list[2][:,2],proj_point_list[2][:,3])
# ax.set_aspect('equal')

In [39]:
textsize = 15
plt.rc('font', size=textsize) 
# %matplotlib inline
# bin profile output in sections with width xd to calculate percentiles
dx = 10
# offset = 0.2
grid_size = 1000
clims = [-3, 3]
lon_lims = [110.436, 110.445]
lat_lims = [-7.540, -7.534]

colours = ['tab:blue','tab:orange','tab:green','tab:red','tab:purple','black', 'darkgrey']
labels = [f'r:58, a:28', f'r:140, a:68 (+0.2 m)', f'r:224, a: 108 (+0.4 m)', f'r:306, a:148 (+0.6 m)', f'r:388, a: 188 (+0.8 m)', f'MKA 1-5 (+2 m)', f'MKA 1-3 (+2.2 m)']
offsets = [0, 0.2, 0.4, 0.6, 0.8, 2, 2.2]


fig = plt.figure(figsize=(15,8))

gs = GridSpec(4, 4, figure=fig,height_ratios=[15,15,10,10])

ax00 = fig.add_subplot(gs[0, 0]) # zoom out
ax01 = fig.add_subplot(gs[0, 1]) # win 1
ax02 = fig.add_subplot(gs[0, 2]) # win 2
ax10 = fig.add_subplot(gs[1, 0]) # win 3
ax11 = fig.add_subplot(gs[1, 1]) # win 4
ax12 = fig.add_subplot(gs[1, 2]) # win 5

ax03 = fig.add_subplot(gs[0, 3]) # mka 1-5
ax13 = fig.add_subplot(gs[1, 3]) # mka 1-3
ax2  = fig.add_subplot(gs[2:, :]) # swath profile

obj = example_pairs[0].Stack[2]

zoom_lon_lims = [110.428, 110.45]
zoom_lat_lims = [-7.545, -7.5305]
plot_data = ax00.hexbin(obj.Lon_off.flatten(),obj.Lat_off.flatten(),C=obj.A_off.flatten(),gridsize=grid_size,cmap=cmap,vmin=clims[0],vmax=clims[1])
ax00.set_xlim(zoom_lon_lims)
ax00.set_ylim(zoom_lat_lims)
ax00.set_aspect('equal', 'box')
ax00.add_artist(ScaleBar(110123.8348,location='lower left'))
# axes[0].set_axis_off()
# cbar = plt.colorbar(plot_data,ax=ax)
# cbar.set_label('Range offset [m]')
ax00.plot(np.asarray(buffer_poly.exterior.coords)[:,0],np.asarray(buffer_poly.exterior.coords)[:,1],color='black')
ax00.plot(np.asarray(line_coords)[:,0],np.asarray(line_coords[:,1]),color='red')
# ax.set_axis_off()
ax00.get_xaxis().set_visible(False)
ax00.get_yaxis().set_visible(False)
ax00.plot(coords_L1888[:,0],coords_L1888[:,1],linewidth=2,color='tab:blue',label='L1888')
ax00.plot(coords_L1992[:,0],coords_L1992[:,1],linewidth=2,color='tab:purple',label='L1992')
ax00.plot(coords_L1997[:,0],coords_L1997[:,1],linewidth=2,color='tab:olive',label='L1997')
ax00.plot(coords_L1998[:,0],coords_L1998[:,1],linewidth=2,color='tab:green',label='L1998')
ax00.plot(coords_CRATER[:,0],coords_CRATER[:,1],linewidth=2,color='black',linestyle='--',label='Crater rim')
ax00.plot([lon_lims[0],lon_lims[0],lon_lims[1],lon_lims[1],lon_lims[0]],[lat_lims[0],lat_lims[1],lat_lims[1],lat_lims[0],lat_lims[0]],linewidth=2,color='red')


for (ax, obj,colour) in zip([ax01,ax02,ax10,ax11,ax12],example_pairs[0].Stack,colours):
    plot_data = ax.hexbin(obj.Lon_off.flatten(),obj.Lat_off.flatten(),C=obj.A_off.flatten(),gridsize=grid_size,cmap=cmap,vmin=clims[0],vmax=clims[1])
    ax.set_xlim(lon_lims)
    ax.set_ylim(lat_lims)
    ax.set_aspect('equal', 'box')
    ax.add_artist(ScaleBar(110123.8348,location='lower left'))
    # axes[0].set_axis_off()
    # cbar = plt.colorbar(plot_data,ax=ax)
    # cbar.set_label('Range offset [m]')
    ax.plot(np.asarray(buffer_poly.exterior.coords)[:,0],np.asarray(buffer_poly.exterior.coords)[:,1],color='black')
    ax.plot(np.asarray(line_coords)[:,0],np.asarray(line_coords[:,1]),color='red')
    # ax.set_axis_off()
    ax.get_xaxis().set_visible(False)
    ax.get_yaxis().set_visible(False)
    ax.plot(coords_L1888[:,0],coords_L1888[:,1],linewidth=2,color='tab:blue',label='L1888')
    ax.plot(coords_L1992[:,0],coords_L1992[:,1],linewidth=2,color='tab:purple',label='L1992')
    ax.plot(coords_L1997[:,0],coords_L1997[:,1],linewidth=2,color='tab:olive',label='L1997')
    ax.plot(coords_L1998[:,0],coords_L1998[:,1],linewidth=2,color='tab:green',label='L1998')
    ax.plot(coords_CRATER[:,0],coords_CRATER[:,1],linewidth=2,color='black',linestyle='--',label='Crater rim')
    ax.spines['bottom'].set_color(colour)
    ax.spines['top'].set_color(colour)
    ax.spines['left'].set_color(colour)
    ax.spines['right'].set_color(colour)
    [ax.spines[i].set_linewidth(2) for i in ax.spines]

ax03.hexbin(example_pairs[0].win_13_Lon.flatten(),example_pairs[0].win_13_lat.flatten(),C=example_pairs[0].win_13_A_off.flatten(),gridsize=grid_size,cmap=cmap,vmin=clims[0],vmax=clims[1])
ax03.set_xlim(lon_lims)
ax03.set_ylim(lat_lims)
ax03.set_aspect('equal', 'box')
ax03.add_artist(ScaleBar(110123.8348,location='lower left'))

# cbar = plt.colorbar(plot_data,ax=ax03)
# cbar.set_label('Range offset [m]')
ax03.plot(np.asarray(buffer_poly.exterior.coords)[:,0],np.asarray(buffer_poly.exterior.coords)[:,1],color='black')
ax03.plot(np.asarray(line_coords)[:,0],np.asarray(line_coords[:,1]),color='red')
ax03.plot(coords_L1888[:,0],coords_L1888[:,1],linewidth=2,color='tab:blue',label='L1888')
ax03.plot(coords_L1992[:,0],coords_L1992[:,1],linewidth=2,color='tab:purple',label='L1992')
ax03.plot(coords_L1997[:,0],coords_L1997[:,1],linewidth=2,color='tab:olive',label='L1997')
ax03.plot(coords_L1998[:,0],coords_L1998[:,1],linewidth=2,color='tab:green',label='L1998')
ax03.plot(coords_CRATER[:,0],coords_CRATER[:,1],linewidth=2,color='black',linestyle='--',label='Crater rim')
ax03.spines['bottom'].set_color('black')
ax03.spines['top'].set_color('black')
ax03.spines['left'].set_color('black')
ax03.spines['right'].set_color('black')
[ax03.spines[i].set_linewidth(2) for i in ax03.spines]
ax03.get_xaxis().set_visible(False)
ax03.get_yaxis().set_visible(False)

ax13.hexbin(example_pairs[0].win_15_Lon.flatten(),example_pairs[0].win_15_lat.flatten(),C=example_pairs[0].win_15_A_off.flatten(),gridsize=grid_size,cmap=cmap,vmin=clims[0],vmax=clims[1])
ax13.set_xlim(lon_lims)
ax13.set_ylim(lat_lims)
ax13.set_aspect('equal', 'box')
ax13.add_artist(ScaleBar(110123.8348,location='lower left'))
# add_right_cax(ax13,0.05,0.02)
# cbar = plt.colorbar(plot_data,ax=ax13)
# cbar.set_label('Range offset [m]')
ax13.plot(np.asarray(buffer_poly.exterior.coords)[:,0],np.asarray(buffer_poly.exterior.coords)[:,1],color='black')
ax13.plot(np.asarray(line_coords)[:,0],np.asarray(line_coords[:,1]),color='red')

ax13.plot(coords_L1888[:,0],coords_L1888[:,1],linewidth=2,color='tab:blue',label='L1888')
ax13.plot(coords_L1992[:,0],coords_L1992[:,1],linewidth=2,color='tab:purple',label='L1992')
ax13.plot(coords_L1997[:,0],coords_L1997[:,1],linewidth=2,color='tab:olive',label='L1997')
ax13.plot(coords_L1998[:,0],coords_L1998[:,1],linewidth=2,color='tab:green',label='L1998')
ax13.plot(coords_CRATER[:,0],coords_CRATER[:,1],linewidth=2,color='black',linestyle='--',label='Crater rim')
ax13.spines['bottom'].set_color('darkgrey')
ax13.spines['top'].set_color('darkgrey')
ax13.spines['left'].set_color('darkgrey')
ax13.spines['right'].set_color('darkgrey')
[ax13.spines[i].set_linewidth(2) for i in ax13.spines]
ax13.get_xaxis().set_visible(False)
ax13.get_yaxis().set_visible(False)


for i,(proj_point,colour,label, offset) in enumerate(zip(proj_point_list,colours,labels,offsets)):
    max_dist = proj_point_list[i].max()
    print(max_dist)
    edges = np.arange(0,max_dist,dx)
    profile_stats = np.empty(shape=(edges.shape[0]-1, 3), dtype=float) # pre-alloc nd-array
    for bin_id in enumerate(edges[:-1]):
        sel = np.squeeze(np.asarray([(proj_point[:,2]>=edges[bin_id[0]]) & (proj_point[:,2]<=edges[bin_id[0]+1])]))
        profile_stats[bin_id[0],:] = [np.nanpercentile(proj_point[sel,3],2.5),
                                np.nanmean(proj_point[sel,3]),
                                np.nanpercentile(proj_point[sel,3],97.5)]


    print(profile_stats)


    ax2.fill_between(edges[:-1]+dx/2 , profile_stats[:,0]+offset,profile_stats[:,2]+offset,alpha=0.3,color=colour)
    ax2.scatter(edges[:-1]+dx/2, profile_stats[:,1]+offset,marker='.',color=colour,label=label)
    ax2.set_xlabel('Distance along profile [m]')
    ax2.set_ylabel('Range offset [m]')
    # ax0.scatter(proj_point[:,2],proj_point[:,3],marker='.')
    ax2.legend(borderpad=0.1,labelspacing=0.2,ncol=2,frameon=False,markerscale=3,handletextpad=0.4,columnspacing=1)
    ax2.set_ylim([-2.5,3])
    # plt.show()  
plt.subplots_adjust(wspace=0.03,hspace=0.1)

# plt.savefig('/Users/markbemelmans/Documents/PhD/projects/Merapi2021/figures/MKA_swath_v2.pdf',dpi=300)      

251.4666024750017
[[-0.5997     -0.31375    -0.02855   ]
 [-0.60195    -0.318875    0.00735   ]
 [-0.54205    -0.42228571 -0.27445   ]
 [-0.531375   -0.44575    -0.17565   ]
 [-0.5016     -0.371      -0.2158    ]
 [-0.46845    -0.37557143 -0.30215   ]
 [-0.503      -0.4422     -0.3204    ]
 [-0.779      -0.4392     -0.2014    ]
 [-0.741525   -0.356375   -0.159275  ]
 [-0.536375   -0.40866667 -0.18275   ]
 [-0.524625   -0.4245     -0.311625  ]
 [-1.78615    -1.26725    -0.538825  ]
 [-2.2971     -1.451      -0.7332    ]
 [-1.52075    -1.12816667 -0.546375  ]
 [-1.5227     -1.19485714 -0.77335   ]
 [-1.33675    -1.12233333 -0.892375  ]
 [-1.3966     -1.15833333 -0.9768    ]
 [-1.1435     -1.0728     -0.917     ]
 [-1.0092     -0.862      -0.6587    ]
 [-1.115      -0.964      -0.7813    ]
 [-0.89135    -0.67       -0.44865   ]
 [-1.254      -1.026      -0.869     ]
 [-1.581125   -1.02466667 -0.447875  ]
 [-1.0376     -0.67644444 -0.2524    ]
 [-1.022      -0.7469     -0.4953    ]]
251.46

In [ ]:
textsize = 15
plt.rc('font', size=textsize) 
# %matplotlib inline
# bin profile output in sections with width xd to calculate percentiles
dx = 10
# offset = 0.2
grid_size = 1000
clims = [-3, 3]
lon_lims = [110.436, 110.445]
lat_lims = [-7.540, -7.534]

colours = ['tab:blue','tab:orange','tab:green','tab:red','tab:purple','black', 'darkgrey']
labels = [f'r:58, a:28', f'r:140, a:68 (+0.2 m)', f'r:224, a: 108 (+0.4 m)', f'r:306, a:148 (+0.6 m)', f'r:388, a: 188 (+0.8 m)', f'MKA 1-5 (+2 m)', f'MKA 1-3 (+2.2 m)']
offsets = [0, 0.2, 0.4, 0.6, 0.8, 2, 2.2]


fig = plt.figure(figsize=(15,8))

gs = GridSpec(4, 4, figure=fig,height_ratios=[15,15,10,10])

ax00 = fig.add_subplot(gs[0, 0]) # zoom out
ax01 = fig.add_subplot(gs[0, 1]) # win 1
ax02 = fig.add_subplot(gs[0, 2]) # win 2
ax10 = fig.add_subplot(gs[1, 0]) # win 3
ax11 = fig.add_subplot(gs[1, 1]) # win 4
ax12 = fig.add_subplot(gs[1, 2]) # win 5

ax03 = fig.add_subplot(gs[0, 3]) # mka 1-5
ax13 = fig.add_subplot(gs[1, 3]) # mka 1-3
ax2  = fig.add_subplot(gs[2:, :]) # swath profile

obj = example_pairs[0].Stack[2]

zoom_lon_lims = [110.428, 110.45]
zoom_lat_lims = [-7.545, -7.5305]
plot_data = ax00.hexbin(obj.Lon_off.flatten(),obj.Lat_off.flatten(),C=obj.R_off.flatten(),gridsize=grid_size,cmap=cmap,vmin=clims[0],vmax=clims[1])
ax00.set_xlim(zoom_lon_lims)
ax00.set_ylim(zoom_lat_lims)
ax00.set_aspect('equal', 'box')
ax00.add_artist(ScaleBar(110123.8348,location='lower left'))
# axes[0].set_axis_off()
# cbar = plt.colorbar(plot_data,ax=ax)
# cbar.set_label('Range offset [m]')
ax00.plot(np.asarray(buffer_poly.exterior.coords)[:,0],np.asarray(buffer_poly.exterior.coords)[:,1],color='black')
ax00.plot(np.asarray(line_coords)[:,0],np.asarray(line_coords[:,1]),color='red')
# ax.set_axis_off()
ax00.get_xaxis().set_visible(False)
ax00.get_yaxis().set_visible(False)
ax00.plot(coords_L1888[:,0],coords_L1888[:,1],linewidth=2,color='tab:blue',label='L1888')
ax00.plot(coords_L1992[:,0],coords_L1992[:,1],linewidth=2,color='tab:purple',label='L1992')
ax00.plot(coords_L1997[:,0],coords_L1997[:,1],linewidth=2,color='tab:olive',label='L1997')
ax00.plot(coords_L1998[:,0],coords_L1998[:,1],linewidth=2,color='tab:green',label='L1998')
ax00.plot(coords_CRATER[:,0],coords_CRATER[:,1],linewidth=2,color='black',linestyle='--',label='Crater rim')
ax00.plot([lon_lims[0],lon_lims[0],lon_lims[1],lon_lims[1],lon_lims[0]],[lat_lims[0],lat_lims[1],lat_lims[1],lat_lims[0],lat_lims[0]],linewidth=2,color='red')


for (ax, obj,colour) in zip([ax01,ax02,ax10,ax11,ax12],example_pairs[0].Stack,colours):
    plot_data = ax.hexbin(obj.Lon_off.flatten(),obj.Lat_off.flatten(),C=obj.R_off.flatten(),gridsize=grid_size,cmap=cmap,vmin=clims[0],vmax=clims[1])
    ax.set_xlim(lon_lims)
    ax.set_ylim(lat_lims)
    ax.set_aspect('equal', 'box')
    ax.add_artist(ScaleBar(110123.8348,location='lower left'))
    # axes[0].set_axis_off()
    # cbar = plt.colorbar(plot_data,ax=ax)
    # cbar.set_label('Range offset [m]')
    ax.plot(np.asarray(buffer_poly.exterior.coords)[:,0],np.asarray(buffer_poly.exterior.coords)[:,1],color='black')
    ax.plot(np.asarray(line_coords)[:,0],np.asarray(line_coords[:,1]),color='red')
    # ax.set_axis_off()
    ax.get_xaxis().set_visible(False)
    ax.get_yaxis().set_visible(False)
    ax.plot(coords_L1888[:,0],coords_L1888[:,1],linewidth=2,color='tab:blue',label='L1888')
    ax.plot(coords_L1992[:,0],coords_L1992[:,1],linewidth=2,color='tab:purple',label='L1992')
    ax.plot(coords_L1997[:,0],coords_L1997[:,1],linewidth=2,color='tab:olive',label='L1997')
    ax.plot(coords_L1998[:,0],coords_L1998[:,1],linewidth=2,color='tab:green',label='L1998')
    ax.plot(coords_CRATER[:,0],coords_CRATER[:,1],linewidth=2,color='black',linestyle='--',label='Crater rim')
    ax.spines['bottom'].set_color(colour)
    ax.spines['top'].set_color(colour)
    ax.spines['left'].set_color(colour)
    ax.spines['right'].set_color(colour)
    [ax.spines[i].set_linewidth(2) for i in ax.spines]

ax03.hexbin(MKA_data_list_list[0][0].Lon_off_MKA_vec,MKA_data_list_list[0][0].Lat_off_MKA_vec,C=MKA_data_list_list[0][0].MKA_R_off_vec,gridsize=grid_size,cmap=cmap,vmin=clims[0],vmax=clims[1])
ax03.set_xlim(lon_lims)
ax03.set_ylim(lat_lims)
ax03.set_aspect('equal', 'box')
ax03.add_artist(ScaleBar(110123.8348,location='lower left'))

# cbar = plt.colorbar(plot_data,ax=ax03)
# cbar.set_label('Range offset [m]')
ax03.plot(np.asarray(buffer_poly.exterior.coords)[:,0],np.asarray(buffer_poly.exterior.coords)[:,1],color='black')
ax03.plot(np.asarray(line_coords)[:,0],np.asarray(line_coords[:,1]),color='red')
ax03.plot(coords_L1888[:,0],coords_L1888[:,1],linewidth=2,color='tab:blue',label='L1888')
ax03.plot(coords_L1992[:,0],coords_L1992[:,1],linewidth=2,color='tab:purple',label='L1992')
ax03.plot(coords_L1997[:,0],coords_L1997[:,1],linewidth=2,color='tab:olive',label='L1997')
ax03.plot(coords_L1998[:,0],coords_L1998[:,1],linewidth=2,color='tab:green',label='L1998')
ax03.plot(coords_CRATER[:,0],coords_CRATER[:,1],linewidth=2,color='black',linestyle='--',label='Crater rim')
ax03.spines['bottom'].set_color('black')
ax03.spines['top'].set_color('black')
ax03.spines['left'].set_color('black')
ax03.spines['right'].set_color('black')
[ax03.spines[i].set_linewidth(2) for i in ax03.spines]
ax03.get_xaxis().set_visible(False)
ax03.get_yaxis().set_visible(False)

ax13.hexbin(MKA_data_list_list[0][1].Lon_off_MKA_vec,MKA_data_list_list[0][1].Lat_off_MKA_vec,C=MKA_data_list_list[0][1].MKA_R_off_vec,gridsize=grid_size,cmap=cmap,vmin=clims[0],vmax=clims[1])
ax13.set_xlim(lon_lims)
ax13.set_ylim(lat_lims)
ax13.set_aspect('equal', 'box')
ax13.add_artist(ScaleBar(110123.8348,location='lower left'))
# add_right_cax(ax13,0.05,0.02)
# cbar = plt.colorbar(plot_data,ax=ax13)
# cbar.set_label('Range offset [m]')
ax13.plot(np.asarray(buffer_poly.exterior.coords)[:,0],np.asarray(buffer_poly.exterior.coords)[:,1],color='black')
ax13.plot(np.asarray(line_coords)[:,0],np.asarray(line_coords[:,1]),color='red')

ax13.plot(coords_L1888[:,0],coords_L1888[:,1],linewidth=2,color='tab:blue',label='L1888')
ax13.plot(coords_L1992[:,0],coords_L1992[:,1],linewidth=2,color='tab:purple',label='L1992')
ax13.plot(coords_L1997[:,0],coords_L1997[:,1],linewidth=2,color='tab:olive',label='L1997')
ax13.plot(coords_L1998[:,0],coords_L1998[:,1],linewidth=2,color='tab:green',label='L1998')
ax13.plot(coords_CRATER[:,0],coords_CRATER[:,1],linewidth=2,color='black',linestyle='--',label='Crater rim')
ax13.spines['bottom'].set_color('darkgrey')
ax13.spines['top'].set_color('darkgrey')
ax13.spines['left'].set_color('darkgrey')
ax13.spines['right'].set_color('darkgrey')
[ax13.spines[i].set_linewidth(2) for i in ax13.spines]
ax13.get_xaxis().set_visible(False)
ax13.get_yaxis().set_visible(False)


for i,(proj_point,colour,label, offset) in enumerate(zip(proj_point_list,colours,labels,offsets)):
    max_dist = proj_point_list[i].max()
    print(max_dist)
    edges = np.arange(0,max_dist,dx)
    profile_stats = np.empty(shape=(edges.shape[0]-1, 3), dtype=float) # pre-alloc nd-array
    for bin_id in enumerate(edges[:-1]):
        sel = np.squeeze(np.asarray([(proj_point[:,2]>=edges[bin_id[0]]) & (proj_point[:,2]<=edges[bin_id[0]+1])]))
        profile_stats[bin_id[0],:] = [np.nanpercentile(proj_point[sel,3],2.5),
                                np.nanmean(proj_point[sel,3]),
                                np.nanpercentile(proj_point[sel,3],97.5)]


    print(profile_stats)


    ax2.fill_between(edges[:-1]+dx/2 , profile_stats[:,0]+offset,profile_stats[:,2]+offset,alpha=0.3,color=colour)
    ax2.scatter(edges[:-1]+dx/2, profile_stats[:,1]+offset,marker='.',color=colour,label=label)
    ax2.set_xlabel('Distance along profile [m]')
    ax2.set_ylabel('Range offset [m]')
    # ax0.scatter(proj_point[:,2],proj_point[:,3],marker='.')
    ax2.legend(borderpad=0.1,labelspacing=0.2,ncol=2,frameon=False,markerscale=3,handletextpad=0.4,columnspacing=1)
    ax2.set_ylim([-0.1,4.5])
    # plt.show()  
plt.subplots_adjust(wspace=0.03,hspace=0.1)

plt.savefig('/Users/markbemelmans/Documents/PhD/projects/Merapi2021/figures/MKA_swath_v2.pdf',dpi=300)      

266.4333296704571
[[-1.47500000e-03  2.01125000e-01  3.09650000e-01]
 [ 1.22725000e-01  2.40000000e-01  3.25200000e-01]
 [ 1.32700000e-01  2.12750000e-01  3.22500000e-01]
 [ 1.55475000e-01  2.05700000e-01  3.05675000e-01]
 [ 1.53750000e-01  1.98571429e-01  2.46200000e-01]
 [ 1.53000000e-01  2.14000000e-01  2.81550000e-01]
 [ 1.79400000e-01  2.39555556e-01  3.10200000e-01]
 [ 1.77800000e-01  2.22285714e-01  2.99350000e-01]
 [ 3.05125000e-01  3.14666667e-01  3.28125000e-01]
 [ 2.52925000e-01  3.07500000e-01  3.43950000e-01]
 [ 2.29200000e-01  5.25888889e-01  1.26300000e+00]
 [ 2.27525000e-01  6.47000000e-01  1.56117500e+00]
 [ 8.86800000e-01  1.58000000e+00  1.96230000e+00]
 [ 1.40260000e+00  1.88900000e+00  2.73680000e+00]
 [ 1.41955000e+00  2.00614286e+00  2.83430000e+00]
 [ 1.42495000e+00  1.71657143e+00  1.85040000e+00]
 [ 1.55660000e+00  1.70555556e+00  1.89900000e+00]
 [ 1.21200000e+00  1.63600000e+00  1.78700000e+00]
 [ 1.77940000e+00  1.80200000e+00  1.81270000e+00]
 [ 1.64560000

1   HIToolbox                           0x00007ff8252b6726 _ZN15MenuBarInstance22EnsureAutoShowObserverEv + 102
2   HIToolbox                           0x00007ff825225ce3 _ZN15MenuBarInstance21UpdateAggregateUIModeE21MenuBarAnimationStylehhh + 1125
3   HIToolbox                           0x00007ff8252b6173 _ZN15MenuBarInstance19SetFullScreenUIModeEjj + 175
4   AppKit                              0x00007ff81ed83287 -[NSApplication _setPresentationOptions:instance:flags:] + 1145
5   AppKit                              0x00007ff81ebd8055 -[NSApplication _updateFullScreenPresentationOptionsForInstance:] + 582
6   CoreFoundation                      0x00007ff81b8ed3d4 __CFNOTIFICATIONCENTER_IS_CALLING_OUT_TO_AN_OBSERVER__ + 137
7   CoreFoundation                      0x00007ff81b98741a ___CFXRegistrationPost_block_invoke + 88
8   CoreFoundation                      0x00007ff81b987369 _CFXRegistrationPost + 536
9   CoreFoundation                      0x00007ff81b8c08f9 _CFXNotificationPost +

: 

In [ ]:
print(MKA_data_list_list[0])

In [ ]:
plt.close('all')

In [ ]:
fig, ax = plt.subplots(1,1)

ax.plot([1,2,3], [1,2,3])

In [ ]:
ax.plot([1,2,3],[3,2,1])